# Pokrytí prevence a mamografického screeningu u žen 45+ podle okresů ČR

Interaktivní analýza nad otevřenými daty ÚZIS (Program prevence a screeningu) a ČSÚ.

**Co notebook odpovídá**

1. Jaký podíl žen 45+ v jednotlivých okresech chodí na **preventivní prohlídky** u praktického lékaře — celkem i po pětiletých věkových skupinách.
2. Jaký podíl žen 45+ absolvuje **screeningové mamografické vyšetření** — celkem i po pětiletých skupinách.
3. **Kam z okresu ženy jezdí na mamograf** (odhad z rozmístění akreditovaných pracovišť — viz varování v kapitole 5).
4. Jestli spolu obě čísla **korelují** — celkově i uvnitř jednotlivých věkových skupin.

Vše je vykresleno na mapě okresů ČR (hranice z RÚIAN / ČÚZK — python obdoba `RCzechia`).

---

### Zdroje dat

| Zdroj | Co dodává | Odkud |
|---|---|---|
| `uzis_pps_mamografie.csv` (PPS-01-02) | počty screeningových mamografií, rok × okres **bydliště** × věk | lokální soubor (ÚZIS) |
| `uzis_pps_prevence_zeny45.csv` (agregát PPS-08-04) | vyšetření + kapitační populace, rok × okres **pracoviště PL** × pohlaví × věk | lokální soubor (ÚZIS) |
| `csu_obyvatele_kraje.csv` | kontrolní součty za ČR a kraje | lokální soubor (ČSÚ, sada `OBY02D`) |
| ČSÚ DataStat API, sada `OBY02D` | **ženy podle okresu, pětileté věkové skupiny, 2010–2024** — jmenovatel pro mamografii | `data.csu.gov.cz` |
| ČÚZK RÚIAN (ArcGIS REST) | polygony okresů + souřadnice obcí | `ags.cuzk.cz` |
| mamo.cz | seznam 75 akreditovaných mamografických pracovišť | `www.mamo.cz/centra/` |

Všechna data, která notebook potřebuje, jsou v repozitáři v `data/`, každý soubor
zabalený zvlášť (`data/<soubor>.zip`); první buňka je rozbalí. Velké zdrojové sady
(výkony NRHZS 2,3 GB, očkování proti covidu, PPS-08-04) v repozitáři nejsou, jen
jejich okresní agregáty, které ze zdrojových sad počítá skript `utils/priprava_dat.py`.
Totéž platí pro data stažená z API (ČSÚ, RÚIAN, mamo.cz): bez souboru v `data/`
se stáhnou znovu.
Podrobný popis všech souborů, jejich původu a úprav je v `ZDROJE_DAT.md`.

## 1 · Nastavení

In [1]:
# každý datový soubor je v repozitáři zabalený zvlášť (data/<soubor>.zip);
# -n rozbalí jen ty, které v data/ ještě nejsou
!unzip -n -q "data/*.zip" -d data



15 archives were successfully processed.


In [2]:
import io, json, math, re, html, warnings
from pathlib import Path

import numpy as np
import pandas as pd
import requests
import plotly.graph_objects as go
import plotly.io as pio
from scipy import stats

warnings.filterwarnings("ignore", category=FutureWarning)
pd.set_option("display.max_columns", 40)
pio.renderers.default = "plotly_mimetype+notebook_connected"  # JupyterLab + nbviewer

BASE   = Path.cwd()
DATA   = BASE / "data"
CACHE  = DATA;                 CACHE.mkdir(exist_ok=True)
OUT    = BASE / "outputs";     OUT.mkdir(exist_ok=True)

F_MAMO    = DATA / "uzis_pps_mamografie.csv"          # ÚZIS PPS-01-02
F_PREV    = DATA / "uzis_pps_prevence_zeny45.csv"     # agregát ÚZIS PPS-08-04, ženy 45+
F_POP     = DATA / "csu_obyvatele_kraje.csv"          # ČSÚ OBY02D, ČR a kraje
F_VOLBY   = DATA / "volby_ps2025_okresy.csv"          # volby do PS 2025 po okresech
F_CHRIPKA = DATA / "uzis_chripka_proockovanost.xlsx"  # ÚZIS NR-28-02
F_COVID   = DATA / "mzcr_covid_davky_zeny45_orp.csv"  # agregát MZ ČR, ženy 45+
F_NRHZS   = DATA / "nrhzs_ukazatele_okresy.csv"       # agregáty ÚZIS NR-04-86 (kap. 8.0)
F_TOKY    = DATA / "nrhzs_mamografie_toky.csv"
# agregáty (F_PREV, F_COVID, F_NRHZS, F_TOKY) vznikají ze zdrojových sad skriptem
# utils/priprava_dat.py, notebook pracuje jen s nimi; viz ZDROJE_DAT.md

ROK = 2024          # referenční rok map a korelací

In [3]:
# ---- barevné role (validovaná paleta, jeden odstín pro sekvenční škálu) ----
SEQ = ["#cde2fb", "#9ec5f4", "#6da7ec", "#3987e5", "#2a78d6",
       "#256abf", "#1c5cab", "#184f95", "#104281", "#0d366b"]
BLUES = [[i / (len(SEQ) - 1), c] for i, c in enumerate(SEQ)]

INK, INK2, MUTED = "#0b0b0b", "#52514e", "#898781"
GRID, AXIS, SURFACE = "#e1e0d9", "#c3c2b7", "#fcfcfb"
S1, S2 = "#2a78d6", "#eb6834"        # kategoriální sloty 1 a 2

# divergentní škála: červená (−) · neutrální šedá (0) · modrá (+), stejně kroků na rameni
DIV = [[0.00, "#7a1f1f"], [0.20, "#b93434"], [0.35, "#e34948"], [0.47, "#f3c7c4"],
       [0.50, "#f0efec"],
       [0.53, "#cde2fb"], [0.65, "#3987e5"], [0.80, "#1c5cab"], [1.00, "#0d366b"]]

FONT = dict(family="system-ui, -apple-system, Segoe UI, sans-serif",
            size=13, color=INK)

def layout(title, subtitle="", **kw):
    """Společné chrome pro všechny grafy: tenké linky, potlačená mřížka."""
    head = f"<b>{title}</b>"
    if subtitle:
        head += f'<br><span style="font-size:12px;color:{INK2}">{subtitle}</span>'
    base = dict(
        title=dict(text=head, x=0.01, xanchor="left", font=dict(size=17)),
        font=FONT, paper_bgcolor=SURFACE, plot_bgcolor=SURFACE,
        margin=dict(l=40, r=20, t=80, b=50),
        hoverlabel=dict(bgcolor="white", bordercolor=AXIS,
                        font=dict(family=FONT["family"], size=12.5)),
        xaxis=dict(gridcolor=GRID, zeroline=False, linecolor=AXIS,
                   ticks="outside", tickcolor=AXIS, tickfont=dict(color=MUTED)),
        yaxis=dict(gridcolor=GRID, zeroline=False, linecolor=AXIS,
                   ticks="outside", tickcolor=AXIS, tickfont=dict(color=MUTED)),
    )
    base.update(kw)
    return base

# Rámec mapy: pevný výřez ČR je spolehlivější než fitbounds,
# které kolem území nechává velké prázdné okraje.
CR_LON, CR_LAT = [12.05, 18.90], [48.50, 51.10]

def mapa_geo(fig, right=0.92):
    fig.update_geos(fitbounds=False, visible=False, projection_type="mercator",
                    lonaxis_range=CR_LON, lataxis_range=CR_LAT, bgcolor=SURFACE,
                    domain=dict(x=[0, right], y=[0, 1]))

def skala(nazev):
    return dict(title=dict(text=nazev, side="top", font=dict(size=11, color=INK2)),
                thickness=12, len=0.72, x=0.97, xanchor="left", y=0.5,
                outlinewidth=0, ticksuffix=" %",
                tickfont=dict(size=11, color=MUTED))

def cz(x, dec=1):
    """Číslo česky: desetinná čárka, mezera po tisících."""
    if pd.isna(x):
        return "–"
    s = f"{x:,.{dec}f}".replace(",", " ").replace(".", ",")
    return s

## 2 · Lokální data ÚZIS

Obě sady mají pětileté věkové skupiny, ale mamografie končí kategorií `85 let a více`,
zatímco prevence má `85–89` a `90+`. Sjednocujeme na devět pásem **45–49 … 85+**
a dopočítáváme souhrn **45+ celkem**.

In [4]:
BANDS = ["45–49", "50–54", "55–59", "60–64", "65–69", "70–74", "75–79", "80–84", "85+"]
TOTAL = "45+ celkem"
BAND_ORDER = [TOTAL] + BANDS

UZIS_TO_BAND = {f"{a}–{a+4} let": f"{a}–{a+4}" for a in range(45, 85, 5)}
UZIS_TO_BAND.update({"85–89 let": "85+", "90 let a více": "85+", "85 let a více": "85+"})

mamo_raw = pd.read_csv(F_MAMO)
prev_raw = pd.read_csv(F_PREV)

mamo = mamo_raw[mamo_raw.vek_nazev.isin(UZIS_TO_BAND)].copy()
mamo["band"] = mamo.vek_nazev.map(UZIS_TO_BAND)
mamo = (mamo.rename(columns={"okres_lau_kod": "lau"})
            .groupby(["rok", "lau", "okres_nazev", "kraj_nazev", "band"], as_index=False)
            ["pocet_vysetreni"].sum())

prev = prev_raw[(prev_raw.pohlavi == "Z")                    # jen ženy
                & (prev_raw.icz_okres_kod != "CZ9999")       # "Neznámo" pryč
                & prev_raw.vek_nazev.isin(UZIS_TO_BAND)].copy()
prev["band"] = prev.vek_nazev.map(UZIS_TO_BAND)
prev = (prev.rename(columns={"icz_okres_kod": "lau"})
            .groupby(["rok", "lau", "okres_nazev", "kraj_nazev", "band"], as_index=False)
            [["populace", "pocet_vysetrenych"]].sum())

OKRES = dict(zip(mamo.lau, mamo.okres_nazev))
KRAJ  = dict(zip(mamo.lau, mamo.kraj_nazev))

print(f"mamografie : {len(mamo):>6} řádků, {mamo.rok.min()}–{mamo.rok.max()}, "
      f"{mamo.lau.nunique()} okresů")
print(f"prevence   : {len(prev):>6} řádků, {prev.rok.min()}–{prev.rok.max()}, "
      f"{prev.lau.nunique()} okresů")
mamo.head(3)

mamografie :  10392 řádků, 2010–2024, 77 okresů
prevence   :   9702 řádků, 2011–2024, 77 okresů


,rok,lau,okres_nazev,kraj_nazev,band,pocet_vysetreni
0,2010,CZ0100,Praha,Hlavní město Praha,45–49,8493
1,2010,CZ0100,Praha,Hlavní město Praha,50–54,8480
2,2010,CZ0100,Praha,Hlavní město Praha,55–59,10025


In [5]:
# Třetí lokální soubor (ČSÚ, kraje) — použijeme ho jako nezávislou kontrolu
# věkové struktury a jako kontext; okresní detail dotáhneme z téže sady přes API.
pop_kraje = pd.read_csv(F_POP)
pop_kraje = pop_kraje.rename(columns={"ČR, kraje": "uzemi",
                                      "Věkové skupiny (pětileté)": "vek",
                                      "Hodnota": "hodnota", "Rok": "rok"})
print(pop_kraje.Ukazatel.unique(), pop_kraje.rok.unique(), pop_kraje["Pohlaví"].unique())
pop_kraje.head(3)

<StringArray>
['Počet obyvatel k 31. 12. (koncový stav)']
Length: 1, dtype: str [2025] <StringArray>
['Celkem']
Length: 1, dtype: str


,Ukazatel,rok,Pohlaví,uzemi,vek,hodnota,MJ_TEXT,MJ_SYMBOL
0,Počet obyvatel k 31. 12. (koncový stav),2025,Celkem,Česko,Celkem,10915839.0,osoba,os.
1,Počet obyvatel k 31. 12. (koncový stav),2025,Celkem,Česko,0,77842.0,osoba,os.
2,Počet obyvatel k 31. 12. (koncový stav),2025,Celkem,Česko,1 - 4,398779.0,osoba,os.


## 3 · Doplňkové zdroje (s cache)

### 3.1 Jmenovatel: ženy podle okresů (ČSÚ)

Dodaný ČSÚ soubor je jen za ČR a kraje a navíc za obě pohlaví dohromady — jako
jmenovatel okresních podílů nestačí. Táhneme proto **stejnou sadu `OBY02D`**
přes DataStat API v členění *okres × pětiletá skupina × rok*, ukazatel
*počet obyvatel k 1. 7. (střední stav)*, pohlaví *ženy*.

Praha v číselníku okresů ČSÚ chybí (je vedena jako kraj `CZ010`), doplňujeme ji
zvlášť a mapujeme na LAU kód `CZ0100`, který používají data ÚZIS.

In [6]:
CSU_AGES = ["410045610050000", "410050610055000", "410055610060000", "410060610065000",
            "410065610070000", "410070610075000", "410075610080000", "410080610085000",
            "410085610090000", "410090610095000", "410095799999000"]
CSU_TO_BAND = {f"{a} - {a+4}": f"{a}–{a+4}" for a in range(45, 85, 5)}
CSU_TO_BAND.update({"85 - 89": "85+", "90 - 94": "85+", "95 a více": "85+"})
YEARS = [str(y) for y in range(2010, ROK + 1)]

def csu_okresy(uzemi_dim, uroven):
    body = {
        "sloupce": [
            {"kodDimenze": "VEK5C", "popis": "nazev", "zdrojPopisu": "NAZEV",
             "filtr": [{"zobrazitPolozky": CSU_AGES}]},
            {"kodDimenze": "CasRB", "popis": "nazev", "zdrojPopisu": "NAZEV",
             "filtr": [{"zobrazitPolozky": YEARS}]}],
        "radky": [{"kodDimenze": uzemi_dim, "popis": "nazev", "zdrojPopisu": "NAZEV",
                   "rozbalitUroven": uroven}],
        "filtryTabulky": [
            {"kodDimenze": "IndicatorType", "popis": "nazev", "zdrojPopisu": "NAZEV",
             "filtrTabulkyKod": "9379"},                     # střední stav k 1. 7.
            {"kodDimenze": "POHL2", "popis": "nazev", "zdrojPopisu": "NAZEV",
             "filtrTabulkyKod": "2"}],                       # ženy
        "nepouziteDimenze": []}
    r = requests.post("https://data.csu.gov.cz/api/dotaz/v1/data/sady/OBY02D/vlastni",
                      params={"format": "CSV", "kodZvlast": "true"}, json=body, timeout=300)
    r.raise_for_status()
    return pd.read_csv(io.StringIO(r.text))

f = CACHE / "csu_zeny_okresy.csv"
if f.exists():
    pop = pd.read_csv(f)
else:
    okresy_ = csu_okresy("Uz3A", "OKRES")
    praha_  = csu_okresy("Uz2", "KRAJ")
    praha_  = praha_[praha_["Uz2"] == "CZ010"].copy()
    praha_["Uz3A"], praha_["Okresy"] = "CZ0100", "Praha"
    pop = pd.concat([okresy_, praha_[okresy_.columns.intersection(praha_.columns)]],
                    ignore_index=True)
    pop.to_csv(f, index=False)

pop = pop.rename(columns={"Uz3A": "lau", "Rok": "rok",
                          "Věkové skupiny (pětileté)": "vek", "Hodnota": "zeny"})
pop["band"] = pop.vek.map(CSU_TO_BAND)
pop = pop.groupby(["rok", "lau", "band"], as_index=False)["zeny"].sum()
print(f"{pop.lau.nunique()} okresů × {pop.rok.nunique()} let × {pop.band.nunique()} pásem")

77 okresů × 15 let × 9 pásem


In [7]:
# Kontrola proti dodanému krajskému souboru: ženy 45+ (API) vs. obyvatelstvo 45+ (soubor)
CSU_C45 = ["45 - 49", "50 - 54", "55 - 59", "60 - 64", "65 - 69", "70 - 74",
           "75 - 79", "80 - 84", "85 - 89", "90 - 94", "95 a více"]
cr_soubor = pop_kraje[(pop_kraje.uzemi == "Česko") & pop_kraje.vek.isin(CSU_C45)].hodnota.sum()
cr_api    = pop[pop.rok == 2024].zeny.sum()
print(f"ČR 45+ celkem (soubor ČSÚ, obě pohlaví, 31. 12. 2025): {cr_soubor:>10,.0f}")
print(f"ČR 45+ ženy    (API ČSÚ, střední stav 2024)          : {cr_api:>10,.0f}")
print(f"podíl žen                                            : {cr_api/cr_soubor:>10.1%}")

ČR 45+ celkem (soubor ČSÚ, obě pohlaví, 31. 12. 2025):  5,387,116
ČR 45+ ženy    (API ČSÚ, střední stav 2024)          :  2,813,434
podíl žen                                            :      52.2%


### 3.2 Hranice okresů (ČÚZK RÚIAN)

Ekvivalent `RCzechia::okresy()` pro Python: vrstva *Okres* z RÚIAN ArcGIS REST,
generalizovaná na ~200 m. Praha v RÚIAN není okres, bereme ji z vrstvy *Obec*.

In [8]:
ARCGIS = "https://ags.cuzk.cz/arcgis/rest/services/RUIAN/MapServer"

f = CACHE / "ruian_okresy.geojson"
if f.exists():
    GEO = json.loads(f.read_text(encoding="utf-8"))
else:
    p = {"where": "1=1", "outFields": "nazev,nutslau", "returnGeometry": "true",
         "outSR": "4326", "maxAllowableOffset": "0.003", "f": "geojson"}
    GEO = requests.get(f"{ARCGIS}/15/query", params=p, timeout=300).json()
    pha = requests.get(f"{ARCGIS}/12/query",
                       params={**p, "where": "kod=554782", "outFields": "nazev"},
                       timeout=300).json()
    for ft in pha["features"]:
        ft["properties"] = {"nazev": "Praha", "nutslau": "CZ0100"}
    GEO["features"] += pha["features"]
    f.write_text(json.dumps(GEO, ensure_ascii=False), encoding="utf-8")

def _area(ring):
    return sum(x1 * y2 - x2 * y1 for (x1, y1), (x2, y2) in zip(ring, ring[1:])) / 2

def fix_winding(geom):
    """Sjednotí orientaci prstenců na vnější = po směru hodinových ručiček,
    díry = proti směru.

    Plotly kreslí polygony na kouli přes d3-geo a bere plochu *nalevo* od směru
    obcházení prstence. ArcGIS ale vrací prstence podle RFC 7946 (vnější proti
    směru), takže se každý okres vykreslí jako svůj doplněk a z mapy je jedna
    barevná plocha. Přeorientování je levnější než přepisovat celou geometrii."""
    polys = geom["coordinates"] if geom["type"] == "MultiPolygon" else [geom["coordinates"]]
    for poly in polys:
        for k, ring in enumerate(poly):
            if ring[0] != ring[-1]:
                ring.append(ring[0])
            chtena_zaporna = (k == 0)         # vnější prstenec CW, díry CCW
            if (_area(ring) < 0) != chtena_zaporna:
                ring.reverse()

for ft in GEO["features"]:
    ft["id"] = ft["properties"]["nutslau"][:6]
    fix_winding(ft["geometry"])

def centroid(geom):
    """Plošně vážený těžiště (Multi)Polygonu ve stupních."""
    polys = geom["coordinates"] if geom["type"] == "MultiPolygon" else [geom["coordinates"]]
    A = cx = cy = 0.0
    for poly in polys:
        ring, a, sx, sy = poly[0], 0.0, 0.0, 0.0
        for (x1, y1), (x2, y2) in zip(ring, ring[1:]):
            cr = x1 * y2 - x2 * y1
            a, sx, sy = a + cr, sx + (x1 + x2) * cr, sy + (y1 + y2) * cr
        if a:
            A += abs(a / 2); cx += abs(a / 2) * sx / (3 * a); cy += abs(a / 2) * sy / (3 * a)
    return cx / A, cy / A

CENTROID = {ft["id"]: centroid(ft["geometry"]) for ft in GEO["features"]}
assert set(CENTROID) == set(pop.lau), "geometrie a data si neodpovídají"
print(f"{len(GEO['features'])} okresů, geometrie {f.stat().st_size/1e3:.0f} kB")

77 okresů, geometrie 290 kB


### 3.3 Akreditovaná mamografická pracoviště (mamo.cz)

Seznam pracovišť Národního screeningového centra; adresy geokódujeme přes RÚIAN
(obec → LAU kód okresu + těžiště obce).

In [9]:
KRAJ_NUTS = {"Hlavní město Praha": "CZ010", "Středočeský kraj": "CZ020",
             "Jihočeský kraj": "CZ031", "Plzeňský kraj": "CZ032",
             "Karlovarský kraj": "CZ041", "Ústecký kraj": "CZ042",
             "Liberecký kraj": "CZ051", "Královéhradecký kraj": "CZ052",
             "Pardubický kraj": "CZ053", "Kraj Vysočina": "CZ063",
             "Jihomoravský kraj": "CZ064", "Olomoucký kraj": "CZ071",
             "Zlínský kraj": "CZ072", "Moravskoslezský kraj": "CZ080"}

f = CACHE / "mamocz_pracoviste.csv"
if f.exists():
    centra = pd.read_csv(f)
else:
    t = requests.get("https://www.mamo.cz/centra/", timeout=60).text
    tbody = t.split("<tbody>", 1)[1].split("</tbody>", 1)[0]
    rows = []
    for tr in re.findall(r"<tr>(.*?)</tr>", tbody, re.S):
        td = [html.unescape(re.sub(r"<[^>]+>", " ", c)).replace("\xa0", " ")
              for c in re.findall(r"<td[^>]*>(.*?)</td>", tr, re.S)]
        if len(td) < 3:
            continue
        adr = " ".join(td[1].split())
        m = re.search(r"(\d{3} \d{2})\s+(.+)$", adr)
        rows.append({"pracoviste": re.split(r"\s{2,}", td[0].strip())[0].strip(),
                     "adresa": adr, "psc": m.group(1) if m else None,
                     "mesto": m.group(2).strip() if m else None,
                     "kraj": " ".join(td[2].split())})
    centra = pd.DataFrame(rows)
    centra["obec"] = (centra.mesto.str.replace(r"^Praha\s+\d+$", "Praha", regex=True)
                                  .str.replace(r"^Ostrava-.*$", "Ostrava", regex=True))
    centra["kraj_nuts"] = centra.kraj.map(KRAJ_NUTS)

    where = " OR ".join("nazev='%s'" % n.replace("'", "''") for n in centra.obec.unique())
    gj = requests.get(f"{ARCGIS}/12/query",
                      params={"where": where, "outFields": "nazev,nutslau",
                              "returnGeometry": "true", "outSR": "4326",
                              "maxAllowableOffset": "0.01", "f": "geojson"}, timeout=300).json()
    obce = pd.DataFrame([{"obec": ft["properties"]["nazev"],
                          "obec_lau": ft["properties"]["nutslau"][:6],
                          "obec_kraj": ft["properties"]["nutslau"][:5],
                          "lon": centroid(ft["geometry"])[0],
                          "lat": centroid(ft["geometry"])[1]} for ft in gj["features"]])
    centra = centra.merge(obce, left_on=["obec", "kraj_nuts"],
                          right_on=["obec", "obec_kraj"], how="left")
    centra.to_csv(f, index=False)

assert centra.obec_lau.notna().all(), "některé pracoviště se nepodařilo geokódovat"
print(f"{len(centra)} pracovišť v {centra.obec_lau.nunique()} okresech "
      f"({77 - centra.obec_lau.nunique()} okresů je bez vlastního pracoviště)")
centra[["pracoviste", "mesto", "kraj", "obec_lau"]].head()

75 pracovišť v 53 okresech (24 okresů je bez vlastního pracoviště)


,pracoviste,mesto,kraj,obec_lau
0,AGEL Diagnostické centrum s.r.o. - Nový Jičín,Nový Jičín,Moravskoslezský kraj,CZ0804
1,"AGUR, s.r.o. (Mamografické pracoviště Pelhřimov)",Pelhřimov,Kraj Vysočina,CZ0633
2,"DS radiodiagnostika, s.r.o. (Poliklinika Třebí...",Třebíč,Kraj Vysočina,CZ0634
3,EUC Mamocentrum Bílina,Bílina,Ústecký kraj,CZ0426
4,EUC Mamocentrum Brno,Brno,Jihomoravský kraj,CZ0642


## 4 · Metriky pokrytí

| Metrika | Čitatel | Jmenovatel | Poznámka |
|---|---|---|---|
| `mamo_2y` | mamografie v roce *t* a *t−1* | ženy v okrese (ČSÚ) | screening je **dvouletý**, dvouleté okno je proto hlavní ukazatel |
| `mamo_1y` | mamografie v roce *t* | ženy v okrese (ČSÚ) | roční tempo |
| `prev` | preventivní prohlídky v roce *t* | **kapitační** populace žen | oficiální definice ÚZIS (čitatel i jmenovatel z registrace u PL) |
| `prev_res` | preventivní prohlídky v roce *t* | ženy v okrese (ČSÚ) | jen diagnostika — má **společný jmenovatel** s mamografií, viz kap. 7 |
| `kapitace_index` | kapitační populace | ženy v okrese (ČSÚ) | >1 = okres registruje víc žen, než v něm bydlí |

Dvouleté okno může mírně přestřelit (žena vyšetřená dva roky po sobě se započítá
dvakrát), proto hodnoty nad 100 % nejsou vyloučené.

In [10]:
def s_total(df, cols):
    """Přidá souhrnný řádek 45+ celkem."""
    t = df.groupby(["rok", "lau"], as_index=False)[cols].sum()
    t["band"] = TOTAL
    return pd.concat([df, t], ignore_index=True)

m = s_total(mamo[["rok", "lau", "band", "pocet_vysetreni"]], ["pocet_vysetreni"])
p = s_total(prev[["rok", "lau", "band", "populace", "pocet_vysetrenych"]],
            ["populace", "pocet_vysetrenych"])
z = s_total(pop[["rok", "lau", "band", "zeny"]], ["zeny"])

D = (z.merge(m, on=["rok", "lau", "band"], how="left")
       .merge(p, on=["rok", "lau", "band"], how="left")
       .sort_values(["lau", "band", "rok"]))

D["mamo_predchozi"] = D.groupby(["lau", "band"])["pocet_vysetreni"].shift(1)
D["mamo_1y"]  = 100 * D.pocet_vysetreni / D.zeny
D["mamo_2y"]  = 100 * (D.pocet_vysetreni + D.mamo_predchozi) / D.zeny
D["prev"]     = 100 * D.pocet_vysetrenych / D.populace
D["prev_res"] = 100 * D.pocet_vysetrenych / D.zeny
D["kapitace_index"] = D.populace / D.zeny
D["okres"] = D.lau.map(OKRES)
D["kraj"]  = D.lau.map(KRAJ)
D["band"]  = pd.Categorical(D.band, BAND_ORDER, ordered=True)

print(f"panel {D.shape[0]} řádků  ({D.lau.nunique()} okresů × {D.rok.nunique()} let "
      f"× {len(BAND_ORDER)} pásem)")
(D[D.rok == ROK].groupby("band", observed=True)[["mamo_1y", "mamo_2y", "prev"]]
   .mean().round(1).rename_axis("věkové pásmo")
   .rename(columns={"mamo_1y": "mamograf 1 rok %", "mamo_2y": "mamograf 2 roky %",
                    "prev": "prevence %"}))

panel 11550 řádků  (77 okresů × 15 let × 10 pásem)


,mamograf 1 rok %,mamograf 2 roky %,prevence %
věkové pásmo,,,
45+ celkem,28.1,55.6,59.1
45–49,30.8,62.0,56.9
50–54,32.2,62.3,60.0
55–59,30.4,61.2,59.7
60–64,31.8,62.5,59.6
65–69,31.0,63.0,63.6
70–74,30.0,59.4,62.7
75–79,25.1,48.6,59.2
80–84,15.7,29.4,54.1


## 5 · Kam ženy jezdí na mamograf — odhad

> **Varování.** Dodaná data **neobsahují dvojici „okres bydliště → okres vyšetření“.**
> Sada PPS-01-02 je členěná podle bydliště pojištěnky, nikoli podle poskytovatele,
> takže skutečnou dojížďku z ní odvodit nelze.
>
> Následující čísla jsou **modelový odhad**, ne měření. Gravitační model rozdělí ženy
> z okresu mezi obce s akreditovaným pracovištěm podle vzorce
>
> $$w_{o \to c} \propto n_c^{\alpha}\; e^{-d_{oc}/\tau}$$
>
> kde $n_c$ je počet pracovišť v cílové obci, $d_{oc}$ vzdušná vzdálenost z těžiště
> okresu, $\tau$ = 12 km, $\alpha$ = 0,7 a vzdálenost má dolní mez 6 km (doprava uvnitř
> okresu). Parametry jsou zvolené tak, aby model reprodukoval očekávané chování
> (okres s vlastním pracovištěm si drží většinu, okresy v zázemí velkých měst
> dojíždějí do centra) — **nejsou kalibrované na skutečné toky pacientek.**
> Berte to jako indikaci směru, ne jako podíl.

In [11]:
TAU_KM, ALPHA, D_FLOOR = 12.0, 0.7, 6.0

def haversine(lon1, lat1, lon2, lat2):
    R = 6371.0
    f1, f2 = math.radians(lat1), math.radians(lat2)
    a = (math.sin((f2 - f1) / 2) ** 2
         + math.cos(f1) * math.cos(f2) * math.sin(math.radians(lon2 - lon1) / 2) ** 2)
    return 2 * R * math.asin(math.sqrt(a))

cile = (centra.groupby(["obec", "obec_lau", "lon", "lat"])
              .size().rename("n").reset_index())

def pracoviste():
    """Body obcí s mamografickým pracovištěm (velikost = počet pracovišť) —
    společná vrstva všech map; přidává se jako poslední trace."""
    return go.Scattergeo(
        lon=cile.lon, lat=cile.lat, mode="markers", name="mamografické pracoviště",
        marker=dict(size=8 + 5 * np.sqrt(cile.n - 1), color=S2,
                    line=dict(color=SURFACE, width=2)),
        customdata=np.c_[cile.obec, cile.n],
        hovertemplate="<b>%{customdata[0]}</b><br>pracovišť: %{customdata[1]}<extra></extra>")

LEGENDA_MAPA = dict(x=0.0, y=0.06, xanchor="left", font=dict(size=12),
                    bgcolor="rgba(252,252,251,0.9)", bordercolor=AXIS, borderwidth=1)

toky, nejblizsi = [], []
for lau, (clon, clat) in CENTROID.items():
    d = np.array([haversine(clon, clat, r.lon, r.lat) for r in cile.itertuples()])
    w = (cile.n.values ** ALPHA) * np.exp(-np.maximum(d, D_FLOOR) / TAU_KM)
    w /= w.sum()
    toky.append(pd.DataFrame({"z_lau": lau, "cil_lau": cile.obec_lau.values,
                              "podil": w, "km": d})
                  .groupby(["z_lau", "cil_lau"], as_index=False)
                  .agg(podil=("podil", "sum"), km=("km", "min")))
    i = int(np.argmin(d))
    nejblizsi.append({"lau": lau, "nej_obec": cile.obec.iloc[i], "nej_km": float(d[i]),
                      "vlastni_pracoviste": lau in set(cile.obec_lau)})

TOKY = pd.concat(toky, ignore_index=True)
TOKY["cil_okres"] = TOKY.cil_lau.map(OKRES)
NEJ = pd.DataFrame(nejblizsi)

DOJIZDKA = (TOKY.sort_values("podil", ascending=False).groupby("z_lau").head(3)
                .groupby("z_lau")
                .apply(lambda g: " · ".join(f"{r.cil_okres} {r.podil*100:.0f} %"
                                            for r in g.itertuples()),
                       include_groups=False)
                .rename("dojizdka").reset_index().rename(columns={"z_lau": "lau"}))

prehled = (NEJ.merge(DOJIZDKA, on="lau").assign(okres=lambda d: d.lau.map(OKRES))
              .sort_values("nej_km", ascending=False))
print("Okresy s nejhorší dostupností (nejvzdálenější pracoviště):")
prehled.head(12)[["okres", "nej_obec", "nej_km", "dojizdka"]].round(1)

Okresy s nejhorší dostupností (nejvzdálenější pracoviště):


,okres,nej_obec,nej_km,dojizdka
51,Jindřichův Hradec,Pelhřimov,41.0,Pelhřimov 38 % · České Budějovice 28 % · Jihla...
11,Prachatice,Písek,39.5,Písek 52 % · České Budějovice 38 % · Klatovy 8 %
32,Tábor,Písek,38.7,Písek 28 % · Pelhřimov 27 % · Benešov 16 %
65,Příbram,Beroun,34.7,Praha 32 % · Beroun 24 % · Benešov 14 %
52,Domažlice,Klatovy,30.6,Klatovy 46 % · Plzeň-město 30 % · Tachov 21 %
68,Český Krumlov,České Budějovice,29.5,České Budějovice 93 % · Písek 6 % · Pelhřimov 0 %
18,Mělník,Mladá Boleslav,29.4,Praha 58 % · Mladá Boleslav 14 % · Kladno 8 %
72,Rakovník,Kladno,28.5,Kladno 27 % · Beroun 27 % · Praha 18 %
50,Vyškov,Kyjov,25.4,Brno-město 31 % · Hodonín 15 % · Blansko 14 %
10,Louny,Chomutov,24.6,Chomutov 39 % · Teplice 23 % · Kladno 12 %


## 6 · Mapy okresů

### 6.1 Hlavní mapa — pokrytí v roce 2024

Přepínač nahoře volí metriku, posuvník dole věkové pásmo. Barevná škála se
**mění s pásmem** (jinak by u 85+ splynulo všechno do nejsvětlejšího odstínu) —
rozsah je vždy v popisku škály. Hover ukazuje obě metriky, počet žen, nejbližší
pracoviště a modelový odhad dojížďky.

In [12]:
d = D[D.rok == ROK].merge(NEJ, on="lau").merge(DOJIZDKA, on="lau")
LAUS = sorted(CENTROID)

# jeden řádek na okres, vždy v pořadí LAUS
def rada(band):
    return d[d.band == band].set_index("lau").reindex(LAUS)

# hover nese předformátovaná čísla (české oddělovače) v customdata — při posunu
# pásma se tak přenášejí jen krátká pole místo celého HTML pro 77 okresů
def cdata(band):
    s = rada(band)
    return np.c_[s.okres, s.kraj,
                 [cz(v) for v in s.mamo_2y], [cz(v) for v in s.prev],
                 [cz(v, 0) for v in s.zeny], [cz(v, 0) for v in s.pocet_vysetreni],
                 s.nej_obec, [cz(v, 0) for v in s.nej_km], s.dojizdka]

def htmpl(band):
    return (f"<b>%{{customdata[0]}}</b> · %{{customdata[1]}}"
            f"<br><span style='color:{MUTED}'>ženy {band}</span><br><br>"
            "Mamograf (2 roky): <b>%{customdata[2]} %</b><br>"
            "Preventivní prohlídka: <b>%{customdata[3]} %</b><br>"
            "Žen v okrese: %{customdata[4]}<br>"
            "Mamografií za rok: %{customdata[5]}<br><br>"
            "Nejbližší pracoviště: %{customdata[6]} (%{customdata[7]} km)"
            f"<br><span style='color:{MUTED}'>odhad dojížďky: %{{customdata[8]}}</span>"
            "<extra></extra>")

METRIKY = [("mamo_2y", "Mamografický screening", "podíl žen s vyšetřením za 2 roky"),
           ("prev",    "Preventivní prohlídky",  "podíl žen vyšetřených za rok")]

def rozsah(col, band):
    v = rada(band)[col].dropna()
    return float(np.floor(v.min())), float(np.ceil(v.max()))

fig = go.Figure()
for k, (col, nazev, popis) in enumerate(METRIKY):
    lo, hi = rozsah(col, TOTAL)
    fig.add_trace(go.Choropleth(
        geojson=GEO, locations=LAUS, z=rada(TOTAL)[col],
        customdata=cdata(TOTAL), hovertemplate=htmpl(TOTAL),
        colorscale=BLUES, zmin=lo, zmax=hi, visible=(k == 0),
        marker_line_color=SURFACE, marker_line_width=0.8,
        colorbar=skala(f"{nazev}<br>ženy {TOTAL}"), showlegend=False))
fig.add_trace(pracoviste())

steps = []
for band in BAND_ORDER:
    r0, r1 = rozsah("mamo_2y", band), rozsah("prev", band)
    cd = cdata(band)
    steps.append(dict(
        method="restyle", label=band,
        args=[{"z": [rada(band)["mamo_2y"], rada(band)["prev"]],
               "customdata": [cd, cd], "hovertemplate": [htmpl(band)] * 2,
               "zmin": [r0[0], r1[0]], "zmax": [r0[1], r1[1]],
               "colorbar.title.text": [f"{METRIKY[0][1]}<br>ženy {band}",
                                       f"{METRIKY[1][1]}<br>ženy {band}"]},
              [0, 1]]))                     # jen choroplety, vrstvu pracovišť nechat

fig.update_layout(**layout(
    f"Pokrytí žen 45+ podle okresů, {ROK}",
    "přepínač = metrika · posuvník = věkové pásmo · barevná škála se přepočítává pro každé pásmo"))
mapa_geo(fig)
fig.update_layout(
    height=600, margin=dict(l=10, r=10, t=100, b=90),
    showlegend=True, legend=LEGENDA_MAPA,
    updatemenus=[dict(type="buttons", direction="right", x=1.0, xanchor="right",
                      y=1.14, yanchor="top", showactive=True,
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12),
                      buttons=[dict(label=n, method="update",
                                    args=[{"visible": [i == j for j in range(2)] + [True]}])
                               for i, (_, n, _) in enumerate(METRIKY)])],
    sliders=[dict(active=0, steps=steps, x=0.06, len=0.88, y=0.02, yanchor="top",
                  pad=dict(t=10), currentvalue=dict(prefix="věkové pásmo: ",
                                                    font=dict(size=13, color=INK)),
                  tickcolor=AXIS, font=dict(size=11, color=MUTED))])
fig.write_html(OUT / "mapa_pokryti.html", include_plotlyjs="cdn")
fig

#### Tabulkový pohled (stejná data, WCAG-čistá varianta)

In [13]:
tab = (d[d.band == TOTAL]
       .sort_values("mamo_2y", ascending=False)
       [["okres", "kraj", "zeny", "mamo_2y", "mamo_1y", "prev", "kapitace_index",
         "nej_obec", "nej_km", "dojizdka"]]
       .rename(columns={"zeny": "ženy 45+", "mamo_2y": "mamograf 2 roky %",
                        "mamo_1y": "mamograf 1 rok %", "prev": "prevence %",
                        "kapitace_index": "kapitace/rezidenti",
                        "nej_obec": "nejbližší pracoviště", "nej_km": "km",
                        "dojizdka": "odhad dojížďky (model)"})
       .round({"mamograf 2 roky %": 1, "mamograf 1 rok %": 1, "prevence %": 1,
               "kapitace/rezidenti": 2, "km": 0}))
tab.to_csv(OUT / "okresy_2024.csv", index=False)
D.to_csv(OUT / "panel_okresy_2010_2024.csv", index=False)
tab.head(20)

,okres,kraj,ženy 45+,mamograf 2 roky %,mamograf 1 rok %,prevence %,kapitace/rezidenti,nejbližší pracoviště,km,odhad dojížďky (model)
530,Třebíč,Vysočina,29337.0,67.0,32.3,64.5,1.01,Třebíč,8.0,Třebíč 73 % · Znojmo 8 % · Jihlava 7 %
670,Kroměříž,Zlínský kraj,28749.0,66.2,31.8,59.9,0.94,Kroměříž,3.0,Kroměříž 38 % · Zlín 23 % · Přerov 13 %
630,Olomouc,Olomoucký kraj,62503.0,64.9,32.8,57.9,0.90,Olomouc,10.0,Olomouc 72 % · Přerov 8 % · Prostějov 8 %
520,Pelhřimov,Vysočina,19730.0,64.7,33.0,65.7,1.06,Pelhřimov,5.0,Pelhřimov 78 % · Jihlava 10 % · Havlíčkův Brod...
10,Benešov,Středočeský kraj,26561.0,61.7,30.7,46.6,0.90,Benešov,10.0,Benešov 68 % · Praha 19 % · Pelhřimov 4 %
470,Pardubice,Pardubický kraj,45886.0,61.6,30.9,65.1,0.96,Pardubice,3.0,Pardubice 53 % · Hradec Králové 32 % · Kolín 3 %
370,Česká Lípa,Liberecký kraj,26699.0,61.4,31.0,63.2,0.90,Česká Lípa,5.0,Česká Lípa 67 % · Liberec 7 % · Mladá Boleslav...
750,Opava,Moravskoslezský kraj,46808.0,60.3,31.6,61.9,0.88,Opava,5.0,Opava 51 % · Ostrava-město 23 % · Bruntál 9 %
120,Rakovník,Středočeský kraj,14838.0,60.2,29.4,35.5,0.86,Kladno,29.0,Kladno 27 % · Beroun 27 % · Praha 18 %
30,Kladno,Středočeský kraj,43983.0,60.0,28.6,56.1,0.89,Kladno,6.0,Kladno 52 % · Praha 32 % · Beroun 10 %


### 6.2 Vývoj v čase

Animovaná mapa dvouletého pokrytí mamografickým screeningem, 2011–2024
(rok 2010 slouží jen jako předchozí rok pro dvouleté okno).
Škála je zde **pevná**, aby byl vidět skutečný posun mezi roky.

In [14]:
roky = list(range(2011, ROK + 1))
dt = D[D.band == TOTAL].merge(NEJ, on="lau")

def z_rok(y, col="mamo_2y"):
    return dt[dt.rok == y].set_index("lau").reindex(LAUS)[col]

def txt_rok(y):
    s = dt[dt.rok == y].set_index("lau").reindex(LAUS)
    return [(f"<b>{r.okres}</b><br>{y}<br><br>"
             f"Mamograf (2 roky): <b>{cz(r.mamo_2y)} %</b><br>"
             f"Preventivní prohlídka: {cz(r.prev)} %<br>"
             f"Žen 45+: {cz(r.zeny, 0)}") for r in s.itertuples()]

vmin = float(np.floor(dt.mamo_2y.min())); vmax = float(np.ceil(dt.mamo_2y.max()))

anim = go.Figure(
    data=[go.Choropleth(geojson=GEO, locations=LAUS, z=z_rok(roky[0]), text=txt_rok(roky[0]),
                        hovertemplate="%{text}<extra></extra>", colorscale=BLUES,
                        zmin=vmin, zmax=vmax, marker_line_color=SURFACE,
                        marker_line_width=0.8,
                        colorbar=skala("mamografický screening<br>ženy 45+, 2 roky"),
                        showlegend=False),
          pracoviste()],
    frames=[go.Frame(name=str(y), data=[go.Choropleth(z=z_rok(y), text=txt_rok(y))],
                     traces=[0])
            for y in roky])

anim.update_layout(**layout("Mamografický screening žen 45+ v čase",
                            "dvouleté pokrytí, 2011–2024 · pevná barevná škála"))
mapa_geo(anim)
anim.update_layout(
    height=600, margin=dict(l=10, r=10, t=90, b=90),
    showlegend=True, legend=LEGENDA_MAPA | dict(y=0.12),
    updatemenus=[dict(type="buttons", direction="left", x=0.01, xanchor="left",
                      y=0.04, yanchor="top", showactive=False, bgcolor=SURFACE,
                      bordercolor=AXIS, borderwidth=1, font=dict(size=12),
                      buttons=[dict(label="▶ přehrát", method="animate",
                                    args=[None, dict(frame=dict(duration=650, redraw=True),
                                                     transition=dict(duration=0),
                                                     fromcurrent=True)]),
                               dict(label="❚❚ stop", method="animate",
                                    args=[[None], dict(frame=dict(duration=0, redraw=False),
                                                       mode="immediate")])])],
    sliders=[dict(active=0, x=0.18, len=0.78, y=0.05, yanchor="top",
                  currentvalue=dict(prefix="rok: ", font=dict(size=13, color=INK)),
                  tickcolor=AXIS, font=dict(size=11, color=MUTED),
                  steps=[dict(method="animate", label=str(y),
                              args=[[str(y)], dict(mode="immediate",
                                                   frame=dict(duration=0, redraw=True))])
                         for y in roky])])
anim.write_html(OUT / "mapa_vyvoj.html", include_plotlyjs="cdn")
anim

### 6.3 Dostupnost: kde pracoviště jsou a kam se z okresu jezdí

Body = obce s akreditovaným mamografickým pracovištěm (velikost = počet pracovišť),
podklad = dvouleté pokrytí. 24 ze 77 okresů vlastní pracoviště nemá.

In [15]:
acc = go.Figure()
s = rada(TOTAL)
acc.add_trace(go.Choropleth(
    geojson=GEO, locations=LAUS, z=s.mamo_2y,
    customdata=cdata(TOTAL), hovertemplate=htmpl(TOTAL), colorscale=BLUES,
    marker_line_color=SURFACE, marker_line_width=0.8,
    colorbar=skala("mamografický screening<br>ženy 45+, 2 roky"), showlegend=False))
acc.add_trace(pracoviste())
acc.update_layout(**layout("Rozmístění mamografických pracovišť",
                           f"{len(centra)} akreditovaných pracovišť v {cile.obec_lau.nunique()} "
                           f"z 77 okresů · zdroj mamo.cz"))
mapa_geo(acc)
acc.update_layout(height=600, margin=dict(l=10, r=10, t=90, b=20), showlegend=True,
                  legend=LEGENDA_MAPA)
acc.write_html(OUT / "mapa_pracovist.html", include_plotlyjs="cdn")
acc

In [16]:
g = d[d.band == TOTAL].dropna(subset=["mamo_2y", "nej_km"])
r_acc, p_acc = stats.pearsonr(g.nej_km, g.mamo_2y)

sc = go.Figure()
for má, barva, jmeno in [(True, S1, "má vlastní pracoviště"),
                         (False, S2, "bez vlastního pracoviště")]:
    gg = g[g.vlastni_pracoviste == má]
    sc.add_trace(go.Scatter(
        x=gg.nej_km, y=gg.mamo_2y, mode="markers", name=jmeno,
        marker=dict(size=9, color=barva, line=dict(color=SURFACE, width=2), opacity=0.9),
        customdata=np.c_[gg.okres, gg.kraj],
        hovertemplate=("<b>%{customdata[0]}</b> · %{customdata[1]}<br>"
                       "vzdálenost: %{x:.0f} km<br>pokrytí: %{y:.1f} %<extra></extra>")))
# vybrané popisky: nejvzdálenější a extrémy pokrytí
for _, r in pd.concat([g.nlargest(3, "nej_km"), g.nlargest(2, "mamo_2y"),
                       g.nsmallest(2, "mamo_2y")]).drop_duplicates("lau").iterrows():
    sc.add_annotation(x=r.nej_km, y=r.mamo_2y, text=r.okres, showarrow=False,
                      yshift=14, font=dict(size=11, color=INK2))
sc.update_layout(**layout(
    "Dostupnost pracoviště vysvětluje pokrytí jen minimálně",
    f"Pearson r = {r_acc:.2f} (p = {p_acc:.2f}), {len(g)} okresů, rok {ROK}"))
sc.update_layout(height=500, margin=dict(l=60, r=30, t=80, b=110),
                 xaxis_title="vzdálenost k nejbližšímu pracovišti [km]",
                 yaxis_title="pokrytí mamografií za 2 roky [%]",
                 xaxis_range=[-3, float(g.nej_km.max()) + 7],
                 legend=dict(orientation="h", y=-0.22, yanchor="top", x=0))
sc.write_html(OUT / "dostupnost.html", include_plotlyjs="cdn")
sc

## 7 · Korelace prevence × mamograf

**Na co si dát pozor.** Podíl u prevence má jmenovatel *kapitační populace okresu
pracoviště praktického lékaře*, podíl u mamografie *ženy bydlící v okrese*.
Jde tedy o dvě geograficky ne zcela totožné populace. Alternativa `prev_res`
(prevence dělená rezidentkami) by to srovnala, ale sdílela by jmenovatel
s mamografií a vytvořila by **umělou korelaci** — proto je hlavní ukazatel `prev`
a `prev_res` slouží jen jako citlivostní test.

Sloupec `kapitace_index` ukazuje, jak moc se obě populace v okrese rozcházejí
(Ostrava-město 1,62 = praktici v okrese registrují 1,6× víc žen, než jich tam bydlí).

In [17]:
sc2 = go.Figure()
vis, buttons = [], []
for i, band in enumerate(BAND_ORDER):
    g = d[d.band == band].dropna(subset=["prev", "mamo_2y"])
    r, pv = stats.pearsonr(g.prev, g.mamo_2y)
    k = np.polyfit(g.prev, g.mamo_2y, 1)
    xs = np.linspace(g.prev.min(), g.prev.max(), 2)
    for má, barva, jmeno in [(True, S1, "má vlastní pracoviště"),
                             (False, S2, "bez vlastního pracoviště")]:
        gg = g[g.vlastni_pracoviste == má]
        sc2.add_trace(go.Scatter(
            x=gg.prev, y=gg.mamo_2y, mode="markers", name=jmeno, visible=(i == 0),
            legendgroup=jmeno, showlegend=(i == 0),
            marker=dict(size=9, color=barva, line=dict(color=SURFACE, width=2), opacity=0.9),
            customdata=np.c_[gg.okres, gg.kraj, gg.zeny],
            hovertemplate=("<b>%{customdata[0]}</b> · %{customdata[1]}<br>"
                           "prevence: %{x:.1f} %<br>mamograf: %{y:.1f} %<br>"
                           "žen: %{customdata[2]:,.0f}<extra></extra>")))
    sc2.add_trace(go.Scatter(x=xs, y=np.polyval(k, xs), mode="lines",
                             name="lineární proložení", visible=(i == 0),
                             legendgroup="fit", showlegend=(i == 0),
                             line=dict(color=MUTED, width=2, dash="solid"),
                             hoverinfo="skip"))
    buttons.append(dict(label=band, method="update", args=[
        {"visible": [j // 3 == i for j in range(3 * len(BAND_ORDER))]},
        {"title.text": (f"<b>Preventivní prohlídky vs. mamografický screening — {band}</b>"
                        f'<br><span style="font-size:12px;color:{INK2}">'
                        f"Pearson r = {r:.2f} (p = {pv:.3f}) · 77 okresů · rok {ROK}</span>")}]))

g0 = d[d.band == TOTAL].dropna(subset=["prev", "mamo_2y"])
r0, p0 = stats.pearsonr(g0.prev, g0.mamo_2y)
sc2.update_layout(**layout(f"Preventivní prohlídky vs. mamografický screening — {TOTAL}",
                           f"Pearson r = {r0:.2f} (p = {p0:.3f}) · 77 okresů · rok {ROK}"))
sc2.update_layout(
    height=580, margin=dict(l=60, r=30, t=90, b=110),
    xaxis_title="preventivní prohlídky u PL [% za rok]",
    yaxis_title="mamografický screening [% za 2 roky]",
    legend=dict(orientation="h", y=-0.20, yanchor="top", x=0),
    updatemenus=[dict(type="dropdown", x=1.0, xanchor="right", y=1.17, yanchor="top",
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12), showactive=True, buttons=buttons)])
sc2.write_html(OUT / "korelace_scatter.html", include_plotlyjs="cdn")
sc2

### 7.1 Síla vztahu po věkových pásmech

In [18]:
rows = []
for band in BAND_ORDER:
    g = d[d.band == band].dropna(subset=["prev", "mamo_2y"])
    r, pv = stats.pearsonr(g.prev, g.mamo_2y)
    rs, ps = stats.spearmanr(g.prev, g.mamo_2y)
    gg = g[g.kapitace_index.between(0.9, 1.1)]          # okresy s čistým jmenovatelem
    r_ok, _ = stats.pearsonr(gg.prev, gg.mamo_2y)
    rows.append({"pásmo": band, "n": len(g), "Pearson r": r, "p": pv,
                 "Spearman ρ": rs, "r (kapitace 0,9–1,1)": r_ok, "n_ok": len(gg)})
KOR = pd.DataFrame(rows)
KOR.to_csv(OUT / "korelace_po_pasmech.csv", index=False)
KOR.round(3)

,pásmo,n,Pearson r,p,Spearman ρ,"r (kapitace 0,9–1,1)",n_ok
0,45+ celkem,77,0.121,0.295,0.166,0.256,54
1,45–49,77,0.092,0.424,0.087,0.170,32
2,50–54,77,0.165,0.152,0.234,0.307,50
3,55–59,77,0.131,0.258,0.148,0.256,45
4,60–64,77,0.074,0.523,0.127,0.178,55
5,65–69,77,0.100,0.387,0.113,0.263,55
6,70–74,77,0.106,0.358,0.133,0.150,63
7,75–79,77,0.183,0.112,0.225,0.156,66
8,80–84,77,0.223,0.051,0.311,0.240,63
9,85+,77,0.210,0.067,0.222,0.162,53


In [19]:
bar = go.Figure()
bar.add_trace(go.Bar(
    x=KOR["pásmo"], y=KOR["Pearson r"], name="všech 77 okresů",
    marker=dict(color=S1, line=dict(color=SURFACE, width=2)),
    customdata=np.c_[KOR["p"], KOR["n"]],
    hovertemplate=("<b>%{x}</b><br>r = %{y:.3f}<br>p = %{customdata[0]:.3f}"
                   "<br>n = %{customdata[1]}<extra></extra>")))
bar.add_trace(go.Bar(
    x=KOR["pásmo"], y=KOR["r (kapitace 0,9–1,1)"], name="okresy s čistým jmenovatelem",
    marker=dict(color=S2, line=dict(color=SURFACE, width=2)),
    customdata=np.c_[KOR["n_ok"]],
    hovertemplate="<b>%{x}</b><br>r = %{y:.3f}<br>n = %{customdata[0]}<extra></extra>"))
bar.update_layout(**layout(
    "Korelace prevence × mamograf je slabá ve všech věkových pásmech",
    f"Pearsonovo r mezi okresními podíly, rok {ROK} · |r| < 0,3 = zanedbatelný vztah"))
bar.update_layout(height=460, margin=dict(l=60, r=30, t=80, b=100),
                  barmode="group", bargap=0.3, bargroupgap=0.12,
                  yaxis_title="Pearsonovo r", xaxis_title="",
                  yaxis=dict(range=[-0.1, 0.6], gridcolor=GRID, zeroline=True,
                             zerolinecolor=AXIS, zerolinewidth=1,
                             tickfont=dict(color=MUTED)),
                  legend=dict(orientation="h", y=-0.16, yanchor="top", x=0))
bar.write_html(OUT / "korelace_pasma.html", include_plotlyjs="cdn")
bar

### 7.2 Citlivostní testy

In [20]:
g = d[d.band == TOTAL].dropna(subset=["prev", "mamo_2y"])
testy = [
    ("prevence (kapitační jmenovatel) × mamograf 2 roky",
     *stats.pearsonr(g.prev, g.mamo_2y), len(g)),
    ("totéž, jen okresy s kapitace/rezidenti 0,9–1,1",
     *stats.pearsonr(*[g[g.kapitace_index.between(0.9, 1.1)][c] for c in ("prev", "mamo_2y")]),
     (g.kapitace_index.between(0.9, 1.1)).sum()),
    ("prevence × mamograf 1 rok", *stats.pearsonr(g.prev, g.mamo_1y), len(g)),
    ("prevence dělená rezidentkami × mamograf  ⚠ společný jmenovatel",
     *stats.pearsonr(g.prev_res, g.mamo_2y), len(g)),
    ("vzdálenost k pracovišti × mamograf", *stats.pearsonr(g.nej_km, g.mamo_2y), len(g)),
    ("kapitace/rezidenti × mamograf", *stats.pearsonr(g.kapitace_index, g.mamo_2y), len(g)),
]
T = pd.DataFrame(testy, columns=["test", "r", "p", "n"]).round({"r": 3, "p": 4})

vyvoj = []
for y in range(2012, ROK + 1):
    gy = D[(D.rok == y) & (D.band == TOTAL)].dropna(subset=["prev", "mamo_2y"])
    vyvoj.append({"rok": y, "r": round(stats.pearsonr(gy.prev, gy.mamo_2y)[0], 3)})
print("Korelace 45+ v jednotlivých letech:")
print(pd.DataFrame(vyvoj).set_index("rok").T.to_string())
print()
T

Korelace 45+ v jednotlivých letech:
rok   2012   2013   2014   2015  2016  2017   2018   2019   2020   2021   2022   2023   2024
r   -0.025 -0.059  0.006  0.048  0.05  0.06 -0.005  0.037  0.089  0.006  0.047  0.099  0.121



,test,r,p,n
0,prevence (kapitační jmenovatel) × mamograf 2 roky,0.121,0.2951,77
1,"totéž, jen okresy s kapitace/rezidenti 0,9–1,1",0.256,0.0616,54
2,prevence × mamograf 1 rok,0.133,0.2502,77
3,prevence dělená rezidentkami × mamograf ⚠ spo...,0.102,0.3776,77
4,vzdálenost k pracovišti × mamograf,-0.074,0.5249,77
5,kapitace/rezidenti × mamograf,0.039,0.7351,77


## 8 · Socioekonomický kontext okresů

Pokud pokrytí nevysvětluje ani prevence, ani vzdálenost k pracovišti, nabízí se
otázka, jestli ho nevysvětluje **složení obyvatelstva okresu**. Stahujeme proto
sadu okresních ukazatelů z ČSÚ a sčítání 2021.

| Oblast | Ukazatel | Zdroj (sada) |
|---|---|---|
| trh práce | podíl nezaměstnaných žen | ČSÚ `NEZ01` |
| chudoba / dávky | dávky SSP a příspěvek na bydlení na obyvatele | ČSÚ `SZB02` |
| zdravotní znevýhodnění | příjemkyně invalidního důchodu | ČSÚ `SZB08` |
| cizinci | ženy s cizím občanstvím | ČSÚ `CIZ001` |
| majetek | průměrná kupní cena bytů a domů (Kč/m²) | ČSÚ `CEN0402` |
| urbanizace | hustota zalidnění | ČSÚ `RSO08` |
| demografie | průměrný věk žen, podíl 65+, migrační saldo | ČSÚ `OBY02F`, `OBY06` |
| zdraví | podíl úmrtí žen na novotvary | ČSÚ `OBY04K` |
| vzdělání | podíl VŠ a podíl jen se základním vzděláním (ženy 15+) | SLDB 2021 `SLDZOB04` |
| ekonomická aktivita | ženy mimo pracovní sílu | SLDB 2021 `SLDZOB13` |
| rodinný stav | vdovy a rozvedené | SLDB 2021 `SLDZOB03` |
| bydlení | osoby mimo byty a bez domova | SLDB 2021 `SLDZOB11` |
| sídelní struktura | podíl obyvatel okresu žijících v obcích pěti velikostních tříd | SLDB 2021 `SLDZOB01` |
| dostupnost | má okres mamografické pracoviště (0/1) a vzdálenost k nejbližšímu | mamo.cz + kap. 5 |
| zdravotní péče | skutečná dojížďka na screeningovou mamografii, preventivní gynekologické prohlídky, výkony na obyvatele | ÚZIS NR-04-86 (lokální soubor) |
| volby | podíl hlasů sedmi stran ve volbách do PS 2025 | `volby_ps2025_okresy.csv` (lokální soubor) |

**Volební výsledky bereme jako hrubý souhrnný ukazatel** toho, jak se okres liší
sociálně a hodnotově — jedno číslo v sobě nese příjmy, vzdělání, věk i důvěru
v instituce. Nejde o tvrzení o voličích jednotlivých stran: korelace je
**ekologická**, počítá se přes okresy, a z chování okresu nelze usuzovat na
chování jednotlivce (ekologický klam).

**Čeho se nepodařilo dosáhnout.** Přímý ukazatel příjmové chudoby (SILC) ČSÚ
publikuje jen za kraje — vzorek na okresy nestačí. Podíl osob v exekuci na okres
existoval na `mapaexekuci.cz`, ten projekt ale skončil (doména dnes hostuje cizí
obsah) a jeho nástupce `mapazadluzeni.cz` nemá strojově čitelný export.
Chudobu proto zastupují dávky, nezaměstnanost, ceny nemovitostí a vzdělání.
Struktura uchazeček podle délky evidence (`NEZ02`) není v DataStatu za okresy
naplněná, proto chybí ukazatel dlouhodobé nezaměstnanosti.

Sčítání dává jen krajské členění, okresní hodnoty proto **skládáme z obcí**
(SLDB obecní úroveň → součet přes okres podle RÚIAN).

In [21]:
CSU_API = "https://data.csu.gov.cz/api/dotaz/v1/data/sady/{}/vlastni"

def dim(kod, polozky=None, jedna=None, uroven=None):
    d = {"kodDimenze": kod, "popis": "nazev", "zdrojPopisu": "NAZEV"}
    if polozky is not None:
        d["filtr"] = [{"zobrazitPolozky": list(polozky)}]
    if jedna is not None:
        d["filtrTabulkyKod"] = jedna
    if uroven is not None:
        d["rozbalitUroven"] = uroven
    return d

def _dotaz(sada, uzemi, sloupce, filtry, uroven, timeout=600):
    body = {"radky": [dim(uzemi, uroven=uroven)], "sloupce": sloupce,
            "filtryTabulky": filtry, "nepouziteDimenze": []}
    r = requests.post(CSU_API.format(sada), json=body, timeout=timeout,
                      params={"format": "CSV", "kodZvlast": "true"})
    if r.status_code != 200:
        raise RuntimeError(f"{sada}: {r.status_code} {r.text[:160]}")
    return pd.read_csv(io.StringIO(r.text))

def csu(sada, uzemi, sloupce, filtry, praha=None):
    '''Okresní řez sadou. Hierarchická územní dimenze se vrací rozpadlá do
    sloupců <kod>.STAT/.KRAJ/.OKRES; Prahu, kterou číselník okresů ČSÚ někdy
    nezná, dobereme z krajské úrovně.'''
    df = _dotaz(sada, uzemi, sloupce, filtry, "OKRES")
    if uzemi in df.columns:
        df = df.rename(columns={uzemi: "lau"})
    else:
        okr, kraj = f"{uzemi}.OKRES", f"{uzemi}.KRAJ"
        df["lau"] = df[okr]
        if "CZ0100" not in set(df.lau.dropna()) and kraj in df.columns:
            df.loc[df.lau.isna() & (df[kraj] == "CZ010"), "lau"] = "CZ0100"
    df = df.dropna(subset=["lau"])
    df = df[df.lau.astype(str).str.len() == 6]
    if praha and "CZ0100" not in set(df.lau):
        pha = _dotaz(sada, praha, sloupce, filtry, "KRAJ")
        col = praha if praha in pha.columns else f"{praha}.KRAJ"
        pha = pha[pha[col] == "CZ010"].copy()
        pha["lau"] = "CZ0100"
        df = pd.concat([df, pha[df.columns.intersection(pha.columns)]],
                       ignore_index=True)
    return df

def piv(df, sloupec):
    '''Pivot s kódy jako textem — číselné kódy by pandas převedl na int.'''
    d = df.copy()
    d[sloupec] = d[sloupec].astype(str)
    return d.pivot_table(index="lau", columns=sloupec, values="Hodnota")

In [22]:
# --- obce -> okresy (RÚIAN), potřeba pro skládání dat ze sčítání ---
f = CACHE / "ruian_obce_okresy.csv"
if f.exists():
    OBCE = pd.read_csv(f, dtype={"kod": str})
else:
    j = requests.get(f"{ARCGIS}/12/query",
                     params={"where": "1=1", "outFields": "kod,nutslau",
                             "returnGeometry": "false", "f": "json",
                             "resultRecordCount": "10000"}, timeout=300).json()
    OBCE = pd.DataFrame([x["attributes"] for x in j["features"]])
    OBCE["kod"] = OBCE.kod.astype(str)
    OBCE["lau"] = OBCE.nutslau.str[:6]
    OBCE = OBCE[["kod", "lau"]]
    OBCE.to_csv(f, index=False)

def sldb(sada, dimenze, polozky, ukazatel="3162SLDB", pohlavi="2", extra=None):
    '''SLDB 2021 na úrovni obcí, sečtené na okresy.'''
    body = {"radky": [dim("UZ02456H", uroven="OBEC")],
            "sloupce": [dim(dimenze, polozky=polozky)],
            "filtryTabulky": [dim("IndicatorType", jedna=ukazatel),
                              dim("CENROK21", jedna="C20210326"),
                              dim("POHL3", jedna=pohlavi)] + (extra or []),
            "nepouziteDimenze": []}
    r = requests.post(CSU_API.format(sada), json=body, timeout=900,
                      params={"format": "CSV", "kodZvlast": "true"})
    r.raise_for_status()
    d = pd.read_csv(io.StringIO(r.text)).dropna(subset=["UZ02456H.OBEC"])
    d = d[d["UZ02456H.MOMC"].isna()]          # městské části by obce zdvojily
    d["kod"] = d["UZ02456H.OBEC"].astype(int).astype(str)
    d = d.merge(OBCE, on="kod", how="left")
    assert d.lau.notna().all(), "obec bez okresu"
    d[dimenze] = d[dimenze].astype(str)
    return d.pivot_table(index="lau", columns=dimenze, values="Hodnota", aggfunc="sum")

In [23]:
def _populace():
    out = {}
    for kod, jm in [("0", "obyvatel"), ("2", "zeny_celkem")]:
        d = csu("OBY02D", "Uz3A", [dim("VEK5C", polozky=["VEKC"])],
                [dim("IndicatorType", jedna="9379"), dim("CasRB", jedna=str(ROK)),
                 dim("POHL2", jedna=kod)], praha="Uz2")
        out[jm] = d.groupby("lau").Hodnota.sum()
    return pd.DataFrame(out).reset_index()

def _nezam():
    d = csu("NEZ01", "UZ023H2U", [dim("IndicatorType", polozky=["5973DIZ"])],
            [dim("CasR", jedna=str(ROK))])
    return piv(d, "IndicatorType").rename(
        columns={"5973DIZ": "nezam_zeny_pct"}).reset_index()

def _cizinky():
    d = csu("CIZ001", "Uz0123h2jk", [dim("Pohlciz", polozky=["2"])],
            [dim("IndicatorType", jedna="6121"), dim("DRPOVOLPOBYT001", jedna="0"),
             dim("CASR3112", jedna=f"{ROK}-12-31")])
    return d.groupby("lau", as_index=False).Hodnota.sum().rename(
        columns={"Hodnota": "cizinky_pocet"})

def _davky():
    d = csu("SZB02", "Uz023h", [dim("DRUHSOCDAVH1", polozky=["0", "13"])],
            [dim("IndicatorType", jedna="7399H"), dim("CasR", jedna=str(ROK))])
    return piv(d, "DRUHSOCDAVH1").rename(
        columns={"0": "davky_ssp_tisKc", "13": "prisp_bydleni_tisKc"}).reset_index()

def _duchody():
    # "Důchody celkem" ČSÚ podle pohlaví nepublikuje, sčítáme stupně invalidity
    d = csu("SZB08", "UZ023H2U", [dim("DRUHDUCHSOU", polozky=["30", "31", "32"])],
            [dim("IndicatorType", jedna="6095H"), dim("CasR", jedna=str(ROK)),
             dim("Pohlciz", jedna="2")])
    p = piv(d, "DRUHDUCHSOU").fillna(0)
    p["invalidni_duchody_zeny"] = p[["30", "31", "32"]].sum(axis=1)
    return p[["invalidni_duchody_zeny"]].reset_index()

def _ceny():
    d = csu("CEN0402", "Uz023h22", [dim("REPRCENNEM", polozky=["10302", "10602"])],
            [dim("IndicatorType", jedna="7432"), dim("CAS3R1", jedna="2022-2024"),
             dim("VELSKUPOBC", jedna="0")])
    return piv(d, "REPRCENNEM").rename(
        columns={"10302": "cena_dum_Kc_m2", "10602": "cena_byt_Kc_m2"}).reset_index()

def _hustota():
    d = csu("RSO08", "Uz023h3", [dim("IndicatorType", polozky=["5387"])],
            [dim("CasR", jedna=str(ROK))])
    return d.groupby("lau", as_index=False).Hodnota.mean().rename(
        columns={"Hodnota": "hustota_obyv_km2"})

def _vek():
    d = csu("OBY02F", "Uz0123h2",
            [dim("IndicatorType", polozky=["5436", "2406VP65AV"])],
            [dim("CasRB", jedna=str(ROK)), dim("POHL2", jedna="2")])
    return piv(d, "IndicatorType").rename(
        columns={"5436": "prumerny_vek_zeny",
                 "2406VP65AV": "podil_65plus_zeny"}).reset_index()

def _novotvary():
    d = csu("OBY04K", "UZ01234B", [dim("PRICSMRT4", polozky=["C00TD48"])],
            [dim("IndicatorType", jedna="5393PODIL"), dim("CasRB", jedna=str(ROK)),
             dim("POHL2", jedna="2")], praha="Uz02")
    return piv(d, "PRICSMRT4").rename(
        columns={"C00TD48": "umrti_novotvary_zeny_pct"}).reset_index()

def _stehovani():
    d = csu("OBY06", "UZ01234B", [dim("IndicatorType", polozky=["5402"])],
            [dim("CasR", jedna=str(ROK)), dim("POHL2", jedna="0")], praha="Uz2")
    return d.groupby("lau", as_index=False).Hodnota.mean().rename(
        columns={"Hodnota": "migracni_saldo"})

VEL_OBCE = [(0, 500, "do 499 obyv."), (500, 2000, "500–1 999 obyv."),
            (2000, 10000, "2 000–9 999 obyv."), (10000, 50000, "10 000–49 999 obyv."),
            (50000, 10 ** 9, "50 000+ obyv.")]

def _velikost_obci():
    '''Jaký podíl obyvatel okresu žije v obcích které velikosti.

    Počty obyvatel jednotlivých obcí bere ze sčítání 2021 — běžnou populační
    statistiku ČSÚ na obce nepublikuje níž než po SO ORP.'''
    body = {"radky": [dim("UZ02456H", uroven="OBEC")],
            "sloupce": [dim("POHL3", polozky=["0"])],
            "filtryTabulky": [dim("IndicatorType", jedna="3162SLDB"),
                              dim("CENROK21", jedna="C20210326")],
            "nepouziteDimenze": []}
    r = requests.post(CSU_API.format("SLDZOB01"), json=body, timeout=900,
                      params={"format": "CSV", "kodZvlast": "true"})
    r.raise_for_status()
    o = pd.read_csv(io.StringIO(r.text)).dropna(subset=["UZ02456H.OBEC"])
    o = o[o["UZ02456H.MOMC"].isna()]
    o["kod"] = o["UZ02456H.OBEC"].astype(int).astype(str)
    o = o.merge(OBCE, on="kod", how="left")
    assert o.lau.notna().all(), "obec bez okresu"
    o["velikost"] = pd.cut(o.Hodnota, bins=[b[0] for b in VEL_OBCE] + [VEL_OBCE[-1][1]],
                           labels=[b[2] for b in VEL_OBCE], right=False)
    pv = o.pivot_table(index="lau", columns="velikost", values="Hodnota",
                       aggfunc="sum", observed=False).fillna(0)
    pv = 100 * pv.div(pv.sum(axis=1), axis=0)
    pv.columns = [f"obce_{i}_pct" for i in range(len(VEL_OBCE))]
    return pv.reset_index()

def _vzdelani():
    p = sldb("SLDZOB04", "Vzdel5", ["0", "102", "109"], ukazatel="3162SLDB15",
             extra=[dim("VEKSKZAK15", jedna="0")])
    return pd.DataFrame({"vs_zeny_pct": 100 * p["109"] / p["0"],
                         "zakl_vzd_zeny_pct": 100 * p["102"] / p["0"]}).reset_index()

def _aktivita():
    p = sldb("SLDZOB13", "EKONAKTIV2", ["0", "54"])
    return pd.DataFrame(
        {"mimo_pracovni_silu_zeny_pct": 100 * p["54"] / p["0"]}).reset_index()

def _rodina():
    p = sldb("SLDZOB03", "RodStav2", ["0", "3", "4"])
    return pd.DataFrame(
        {"vdovy_rozvedene_pct": 100 * (p["3"] + p["4"]) / p["0"]}).reset_index()

def _bydleni():
    p = sldb("SLDZOB11", "ZPBYDLENIWS", ["0", "55", "7"], pohlavi="0")
    return pd.DataFrame({"mimo_byty_pct": 100 * (p["55"].fillna(0)
                                                 + p["7"].fillna(0)) / p["0"]}).reset_index()

ZDROJE = [("populace", _populace), ("nezaměstnanost", _nezam), ("cizinky", _cizinky),
          ("dávky SSP", _davky), ("invalidní důchody", _duchody),
          ("ceny nemovitostí", _ceny), ("hustota", _hustota),
          ("věkové složení", _vek),
          ("úmrtí na novotvary", _novotvary), ("stěhování", _stehovani),
          ("SLDB velikost obcí", _velikost_obci),
          ("SLDB vzdělání", _vzdelani), ("SLDB ekon. aktivita", _aktivita),
          ("SLDB rodinný stav", _rodina), ("SLDB bydlení", _bydleni)]

f = CACHE / "csu_kovariaty_okresy.csv"
if f.exists():
    KOVR = pd.read_csv(f)
else:
    KOVR = None
    for nazev, fn in ZDROJE:
        try:
            df_ = fn()
            KOVR = df_ if KOVR is None else KOVR.merge(df_, on="lau", how="outer")
            print(f"  ✓ {nazev}")
        except Exception as e:
            print(f"  ✗ {nazev}: {type(e).__name__} {str(e)[:90]}")
    KOVR.to_csv(f, index=False)
print(f"{KOVR.shape[1] - 1} surových ukazatelů pro {KOVR.lau.nunique()} okresů")

24 surových ukazatelů pro 77 okresů


### 8.0 Výkony zdravotní péče (NRHZS)

Sada ÚZIS **NR-04-86** obsahuje všechny výkony hrazené z veřejného pojištění
2019–2024 podle kódu výkonu, hlavní diagnózy, zařízení (IČZ), **okresu zařízení**
a **okresu bydliště pacienta**. Neobsahuje pohlaví ani věk, takže ukazatele z ní
platí pro celou populaci okresu (u gynekologie pro všechny ženy).

Soubor má 334 mil. řádků (2,3 GB gz, 19 GB rozbalený), proto v repozitáři není.
Notebook pracuje s jeho okresními agregáty (`nrhzs_ukazatele_okresy.csv`,
`nrhzs_mamografie_toky.csv`), které ze zdrojového `.gz` počítá skript
`utils/priprava_dat.py` přes DuckDB (asi 2 minuty).

| Ukazatel | Výpočet (průměr 2020–2024) |
|---|---|
| dojížďka na screeningovou mamografii | podíl výkonů 89223 u rezidentek okresu, provedených v zařízení v jiném okrese |
| preventivní gynekologické prohlídky | pacientky s výkonem 63050 / ženy v okrese |
| výkony na obyvatele | všechny vykázané výkony / obyvatelé okresu (intenzita čerpání péče) |
| diagnostické zobrazení prsu | radiologické výkony (89xxx kromě screeningu) s diagnózou prsu / 100 žen |
| nezhoubné nálezy prsu | pacientky s D24, N60–N64, R92 / 1 000 žen |
| rakovina prsu | pacientky s C50, D05 / 1 000 žen |
| cytologie děložního čípku | pacientky s výkonem 63417 / ženy |
| test na okultní krvácení | pacienti s výkony 15118–15120 / obyvatelé |
| nemocnost | pacienti s diabetem (E10–E14), hypertenzí (I10–I15), CHOPN (J44), depresí (F32–F33), obezitou (E66) / obyvatelé |

**Počty pacientů s diagnózou jsou dolní odhad.** Jedna pacientka má během roku
řadu různých výkonů a součet přes výkony by ji započítal několikrát. Bereme
proto za každý okres a rok výkon s nejvyšším počtem pacientů dané diagnózy.
Diagnóza se navíc počítá jen tam, kde je vykázaná jako **hlavní**. Hypertenze,
deprese a obezita tak vycházejí výrazně podhodnocené (2024: 1,1 mil., 100 tis.
a 34 tis. pacientů). Pro srovnání okresů mezi sebou to stačí, jako odhad
prevalence ne. Totéž platí pro test na okultní krvácení: tři kódy se vykazují
společně (shodné složení diagnóz), proto bereme největší z nich, ne součet.

**Jak jsme kódy určili.** Sada nese jen kódy výkonů bez názvů. Kód **89223**
(screeningová mamografie) se vykazuje s diagnózou Z12 a jeho roční počty sedí
s PPS-01-02 (2024: 775 tis. proti 787 tis.). **63050** je nejčastější
gynekologický výkon s diagnózou Z01, tedy preventivní prohlídka. Význam diagnóz
potvrzuje číselník MKN-10-CZ (ÚZIS OIS-12-03): Z12 = *Screeningové
vyšetření specializované na novotvary* (Z12.3 = *…na novotvar prsu*), Z01.4 =
*Gynekologické vyšetření (všeobecné)(rutinní)*. Názvy samotných výkonů 89223,
63050, 63417 (cytologie, z poloviny s dg. Z01) a 15118–15120 (test na okultní
krvácení, s dg. Z12) je vhodné ještě ověřit v číselníku zdravotních výkonů MZ ČR.

**Co je tu nového.** Dojížďka je poprvé **měřená**, ne odhadnutá. Gravitační
model z kap. 5 s ní níže porovnáváme.

In [24]:
# NR-04-86 (334 mil. řádků) v repozitáři není; notebook čte jen jeho okresní agregáty,
# které z ní počítá utils/priprava_dat.py (kódy výkonů a diagnóz jsou popsané tam)
ROKY_V = range(ROK - 4, ROK + 1)
nr = pd.read_csv(F_NRHZS)
NR = (nr[nr.rok.isin(ROKY_V)]
      .pivot_table(index="lau", columns="ukazatel", values="hodnota", aggfunc="mean")
      .rename(columns={"vykony": "vykony_n", "gyn_prevence": "gyn_prevence_n",
                       "cytologie": "cytologie_n", "toks": "toks_n", "diag_prs": "diag_prs_n"}))

tk = pd.read_csv(F_TOKY)
TOKY_MER = tk[tk.rok.isin(ROKY_V)].groupby(["z_lau", "cil_lau"], as_index=False).mnozstvi.sum()
TOKY_MER["podil"] = TOKY_MER.mnozstvi / TOKY_MER.groupby("z_lau").mnozstvi.transform("sum")
doma = TOKY_MER[TOKY_MER.z_lau == TOKY_MER.cil_lau].set_index("z_lau").podil

VYK = (NR.assign(dojizdka_mamo_pct=100 * (1 - doma.reindex(NR.index).fillna(0)))  # bez mamografie doma = 100 %
         .rename_axis("lau").reset_index())
assert len(VYK) == 77, f"{len(VYK)} okresů"

# měřená dojížďka vs. gravitační model z kap. 5 (podíl mimo vlastní okres)
model_mimo = 100 * (1 - TOKY.set_index(["z_lau", "cil_lau"]).podil
                    .reindex(list(zip(LAUS, LAUS))).fillna(0).values)
cmp_ = pd.DataFrame({"lau": LAUS, "model": model_mimo}).merge(VYK, on="lau")
r_tok = stats.pearsonr(cmp_.model, cmp_.dojizdka_mamo_pct)[0]
print(f"dojížďka mimo okres: medián {VYK.dojizdka_mamo_pct.median():.0f} %, "
      f"rozpětí {VYK.dojizdka_mamo_pct.min():.0f}–{VYK.dojizdka_mamo_pct.max():.0f} %")
print(f"gravitační model (kap. 5) vs. měření: r = {r_tok:.2f}")
VYK.assign(okres=VYK.lau.map(OKRES)).sort_values("dojizdka_mamo_pct").round(1).head(8)

dojížďka mimo okres: medián 21 %, rozpětí 1–100 %
gravitační model (kap. 5) vs. měření: r = 0.77


ukazatel,lau,chopn,cytologie_n,deprese,diabetes,diag_prs_n,gyn_prevence_n,hypertenze,nezhoubne_prs,obezita,rakovina_prs,toks_n,vykony_n,dojizdka_mamo_pct,okres
22,CZ0323,1966.2,49001.0,2595.4,14696.0,8325.0,39625.2,19209.6,7571.6,566.0,1952.0,9798.6,16575571.4,0.9,Plzeň-město
13,CZ0311,1511.2,59244.2,2172.6,12713.0,6019.8,45186.0,20252.6,2326.0,395.0,2229.2,11925.2,16708586.0,1.5,České Budějovice
63,CZ0712,2215.0,85095.0,1683.2,18390.8,14881.4,54097.2,25985.4,4752.6,930.0,2381.0,15601.4,22261708.8,1.5,Olomouc
36,CZ0427,1862.0,36130.2,2392.0,9258.0,4531.2,24874.6,14937.0,2663.0,408.2,1190.6,7450.6,11721795.6,1.7,Ústí nad Labem
76,CZ0806,4817.2,102620.2,1954.2,28842.0,15543.4,68033.2,31295.2,5187.2,1490.6,3036.6,19860.2,28710846.2,2.1,Ostrava-město
56,CZ0642,4577.4,112375.8,3473.8,25531.0,16148.6,79671.0,35763.6,2486.2,743.8,4041.2,21104.2,32816102.0,3.4,Brno-město
41,CZ0521,1202.0,47369.2,1127.6,12100.4,10290.6,34133.4,17292.6,1753.0,464.8,1760.4,8726.4,15183560.8,3.8,Hradec Králové
28,CZ0412,1154.6,33629.2,1052.0,9109.6,2932.0,24900.6,12069.2,1402.0,368.0,1705.0,8361.2,10565847.4,4.7,Karlovy Vary


Absolutní počty převádíme na podíly a na hlavu, aby byly okresy srovnatelné.

In [25]:
KOV = KOVR.copy()
KOV["cizinky_pct"]            = 100 * KOV.cizinky_pocet / KOV.zeny_celkem
KOV["davky_ssp_Kc_obyv"]      = 1000 * KOV.davky_ssp_tisKc / KOV.obyvatel
KOV["prisp_bydleni_Kc_obyv"]  = 1000 * KOV.prisp_bydleni_tisKc / KOV.obyvatel
KOV["invalid_duchod_zeny_pct"] = 100 * KOV.invalidni_duchody_zeny / KOV.zeny_celkem
KOV["migrace_na_1000"]        = 1000 * KOV.migracni_saldo / KOV.obyvatel

# --- výkony zdravotní péče (kap. 8.0) ---
KOV = KOV.merge(VYK, on="lau", how="left")
KOV["gyn_prevence_pct"] = 100 * KOV.gyn_prevence_n / KOV.zeny_celkem
KOV["vykony_na_obyv"]   = KOV.vykony_n / KOV.obyvatel
KOV["diag_prs_na100"]       = 100 * KOV.diag_prs_n / KOV.zeny_celkem
KOV["nezhoubne_prs_na1000"] = 1000 * KOV.nezhoubne_prs / KOV.zeny_celkem
KOV["rakovina_prs_na1000"]  = 1000 * KOV.rakovina_prs / KOV.zeny_celkem
KOV["cytologie_pct"]        = 100 * KOV.cytologie_n / KOV.zeny_celkem
KOV["toks_pct"]             = 100 * KOV.toks_n / KOV.obyvatel
for s_ in ("diabetes", "hypertenze", "chopn", "deprese", "obezita"):
    KOV[f"{s_}_pct"] = 100 * KOV[s_] / KOV.obyvatel

# --- volby do Poslanecké sněmovny 2025 (lokální soubor, % platných hlasů) ---
# soubor je ve středoevropském CSV: středník, desetinná čárka, BOM,
# a názvy okresů mají na konci nulovou mezeru (U+200B)
STRANY = ["ANO", "SPOLU", "STAN", "Piráti", "SPD", "AUTO", "Stačilo!"]
volby = pd.read_csv(F_VOLBY, sep=";", decimal=",", encoding="utf-8-sig")
volby.columns = [c.strip() for c in volby.columns]
klic = volby.columns[0]
volby["okres"] = volby[klic].str.replace("\u200b", "", regex=False).str.strip()
volby = volby[volby.okres != "Celkem"]
NA_LAU = {v: k for k, v in OKRES.items()}
volby["lau"] = volby.okres.map(NA_LAU)
chybi = volby[volby.lau.isna()].okres.tolist()
assert not chybi, f"nespárované okresy: {chybi}"
volby = volby.rename(columns={s_: f"volby_{s_.rstrip('!')}_pct" for s_ in STRANY})
KOV = KOV.merge(volby[["lau"] + [f"volby_{s_.rstrip('!')}_pct" for s_ in STRANY]],
                on="lau", how="left")
print(f"volby: {len(volby)} okresů, {len(STRANY)} stran")

# popisky a jednotky pro osy a hover
POPIS = {
    "vs_zeny_pct":                 ("vysokoškolačky, ženy 15+", "%"),
    "zakl_vzd_zeny_pct":           ("jen základní vzdělání, ženy 15+", "%"),
    "nezam_zeny_pct":              ("podíl nezaměstnaných žen", "%"),
    "mimo_pracovni_silu_zeny_pct": ("ženy mimo pracovní sílu", "%"),
    "davky_ssp_Kc_obyv":           ("dávky SSP na obyvatele", "Kč"),
    "prisp_bydleni_Kc_obyv":       ("příspěvek na bydlení na obyvatele", "Kč"),
    "invalid_duchod_zeny_pct":     ("příjemkyně invalidního důchodu", "%"),
    "mimo_byty_pct":               ("osoby mimo byty a bez domova", "%"),
    "cizinky_pct":                 ("ženy s cizím občanstvím", "%"),
    "cena_byt_Kc_m2":              ("kupní cena bytů", "Kč/m²"),
    "cena_dum_Kc_m2":              ("kupní cena domů", "Kč/m²"),
    "hustota_obyv_km2":            ("hustota zalidnění", "obyv./km²"),
    "prumerny_vek_zeny":           ("průměrný věk žen", "let"),
    "podil_65plus_zeny":           ("ženy 65+", "%"),
    "vdovy_rozvedene_pct":         ("vdovy a rozvedené", "%"),
    "migrace_na_1000":             ("migrační saldo", "na 1 000 obyv."),
    "umrti_novotvary_zeny_pct":    ("úmrtí žen na novotvary", "%"),
    "obce_0_pct":                  ("obyvatelé obcí do 499 obyv.", "%"),
    "obce_1_pct":                  ("obyvatelé obcí 500–1 999 obyv.", "%"),
    "obce_2_pct":                  ("obyvatelé obcí 2 000–9 999 obyv.", "%"),
    "obce_3_pct":                  ("obyvatelé obcí 10 000–49 999 obyv.", "%"),
    "obce_4_pct":                  ("obyvatelé obcí 50 000+ obyv.", "%"),
    "ma_mamocentrum":              ("okres má mamografické pracoviště", "0/1"),
    "vzdalenost_km":               ("vzdálenost k nejbližšímu pracovišti", "km"),
    "dojizdka_mamo_pct":           ("mamografie mimo okres bydliště (měřeno)", "%"),
    "gyn_prevence_pct":            ("preventivní gynekologická prohlídka za rok", "% žen"),
    "vykony_na_obyv":              ("zdravotní výkony na obyvatele za rok", "výkonů"),
    "diag_prs_na100":              ("diagnostické zobrazení prsu", "na 100 žen"),
    "nezhoubne_prs_na1000":        ("nezhoubné nálezy prsu", "na 1 000 žen"),
    "rakovina_prs_na1000":         ("léčená rakovina prsu", "na 1 000 žen"),
    "cytologie_pct":               ("cytologie děložního čípku za rok", "% žen"),
    "toks_pct":                    ("test na okultní krvácení za rok", "% obyv."),
    "diabetes_pct":                ("diabetes (dolní odhad)", "% obyv."),
    "hypertenze_pct":              ("hypertenze (dolní odhad)", "% obyv."),
    "chopn_pct":                   ("CHOPN (dolní odhad)", "% obyv."),
    "deprese_pct":                 ("deprese (dolní odhad)", "% obyv."),
    "obezita_pct":                 ("obezita (dolní odhad)", "% obyv."),
    "volby_ANO_pct":               ("volby 2025: ANO", "%"),
    "volby_SPOLU_pct":             ("volby 2025: SPOLU", "%"),
    "volby_STAN_pct":              ("volby 2025: STAN", "%"),
    "volby_Piráti_pct":            ("volby 2025: Piráti", "%"),
    "volby_SPD_pct":               ("volby 2025: SPD", "%"),
    "volby_AUTO_pct":              ("volby 2025: Motoristé", "%"),
    "volby_Stačilo_pct":           ("volby 2025: Stačilo!", "%"),
}

# pokrytí průměrované za 2020–2024 — jeden rok je na 77 okresech dost zašuměný
POKR = (D[(D.band == TOTAL) & D.rok.between(ROK - 4, ROK)]
        .groupby("lau", as_index=False)[["mamo_2y", "prev"]].mean())
X = (POKR.merge(KOV, on="lau")
         .merge(d.loc[d.band == TOTAL, ["lau", "okres", "kraj", "zeny"]], on="lau")
         .merge(NEJ[["lau", "nej_km", "vlastni_pracoviste"]], on="lau"))
X["ma_mamocentrum"] = X.vlastni_pracoviste.astype(int)
X["vzdalenost_km"] = X.nej_km

KOVARIATY = [c for c in POPIS if c in X.columns]
SPOJITE = [c for c in KOVARIATY if c != "ma_mamocentrum"]   # binární do scatteru nepatří
X[["lau", "okres", "kraj", "zeny", "mamo_2y", "prev"] + KOVARIATY].to_csv(
    OUT / "okresy_kovariaty.csv", index=False)
X[["okres", "kraj", "mamo_2y", "prev"] + KOVARIATY].round(1).head(12)

volby: 77 okresů, 7 stran


,okres,kraj,mamo_2y,prev,vs_zeny_pct,zakl_vzd_zeny_pct,nezam_zeny_pct,mimo_pracovni_silu_zeny_pct,davky_ssp_Kc_obyv,prisp_bydleni_Kc_obyv,invalid_duchod_zeny_pct,mimo_byty_pct,cizinky_pct,cena_byt_Kc_m2,cena_dum_Kc_m2,hustota_obyv_km2,prumerny_vek_zeny,podil_65plus_zeny,vdovy_rozvedene_pct,migrace_na_1000,...,dojizdka_mamo_pct,gyn_prevence_pct,vykony_na_obyv,diag_prs_na100,nezhoubne_prs_na1000,rakovina_prs_na1000,cytologie_pct,toks_pct,diabetes_pct,hypertenze_pct,chopn_pct,deprese_pct,obezita_pct,volby_ANO_pct,volby_SPOLU_pct,volby_STAN_pct,volby_Piráti_pct,volby_SPD_pct,volby_AUTO_pct,volby_Stačilo_pct
0,Praha,Hlavní město Praha,49.3,54.1,34.0,8.4,3.1,44.2,5132.8,2161.9,2.1,1.2,24.4,111088.0,107339.0,2817.1,43.3,21.1,22.2,9.3,...,7.1,35.4,85.5,9.7,18.7,20.5,53.6,4.1,6.1,8.1,1.2,1.2,0.3,19.9,33.9,13.4,16.8,5.2,5.2,2.8
1,Benešov,Středočeský kraj,56.3,39.0,15.6,14.7,2.8,53.0,4119.5,915.9,4.1,4.5,6.6,52241.0,49688.0,70.5,44.2,23.8,23.3,7.9,...,100.0,41.0,81.6,11.0,20.5,18.9,51.0,3.9,8.2,9.7,1.4,0.9,0.3,35.3,22.0,12.8,7.9,6.8,7.9,3.7
2,Beroun,Středočeský kraj,57.9,52.5,17.8,14.1,4.3,50.2,4202.6,1089.6,3.1,3.4,9.4,56356.0,49459.0,145.8,42.8,20.7,22.8,10.3,...,7.3,36.3,84.1,9.2,38.9,27.1,53.4,4.7,6.5,8.8,0.9,1.0,0.3,30.1,25.5,13.2,9.6,6.6,7.7,4.1
3,Kladno,Středočeský kraj,57.3,49.0,15.1,16.8,4.7,49.4,4819.5,1802.5,3.3,2.5,10.0,64010.0,55557.0,238.3,44.0,22.1,25.1,10.5,...,10.1,39.4,84.6,8.2,16.3,22.6,56.1,5.1,7.3,11.7,1.2,0.8,0.3,34.4,21.7,11.8,8.8,8.0,7.7,4.0
4,Kolín,Středočeský kraj,51.8,51.8,14.4,16.3,5.5,52.0,4781.2,1475.5,3.0,2.2,8.8,53499.0,46238.0,144.8,43.5,22.4,24.1,7.4,...,16.1,40.7,82.6,13.5,21.6,19.7,57.0,4.7,7.1,11.0,1.7,0.7,0.3,34.7,18.2,16.3,7.5,8.0,8.0,4.1
5,Kutná Hora,Středočeský kraj,51.5,56.1,13.6,15.3,4.9,53.8,4493.9,1347.9,5.4,2.4,8.1,47784.0,49309.0,85.6,44.9,24.5,25.1,5.4,...,100.0,41.0,92.5,13.3,19.3,20.7,54.6,5.0,7.8,13.9,1.5,1.0,0.3,38.4,19.4,12.6,7.3,7.5,7.3,4.1
6,Mělník,Středočeský kraj,51.1,56.2,14.4,16.1,5.1,50.3,4687.4,1534.1,2.9,2.4,9.4,57114.0,51462.0,163.7,43.3,21.5,24.2,8.5,...,100.0,38.4,81.8,8.1,17.3,19.2,55.8,5.3,8.8,11.9,1.1,0.7,0.4,33.8,22.5,11.9,8.7,7.9,8.3,3.7
7,Mladá Boleslav,Středočeský kraj,52.4,61.5,14.8,14.5,3.6,50.3,3617.5,770.3,3.6,2.0,15.5,55008.0,48689.0,134.6,43.1,21.0,23.2,11.0,...,5.8,44.7,73.3,8.8,23.0,18.3,55.6,5.9,7.9,9.1,0.9,0.7,0.4,33.6,21.9,12.6,7.6,8.2,9.1,3.6
8,Nymburk,Středočeský kraj,48.2,56.2,15.3,15.0,4.9,51.2,4773.8,1529.5,3.7,2.0,10.2,53290.0,46131.0,127.2,42.9,21.0,23.5,11.3,...,100.0,39.0,76.3,10.9,22.6,18.1,49.6,5.5,7.2,11.2,0.9,1.0,0.3,32.5,22.3,13.5,9.2,7.5,7.8,3.7
9,Praha-východ,Středočeský kraj,52.2,52.5,24.5,12.0,1.8,48.8,3846.7,817.3,2.5,3.6,12.2,56657.0,92215.0,270.8,40.4,16.8,18.9,11.6,...,100.0,37.0,74.6,8.6,17.5,16.9,51.8,4.3,4.9,7.5,0.8,0.9,0.3,23.0,32.2,15.7,10.4,5.8,7.4,2.6


### 8.1 Mapa vybraných ukazatelů

Rozbalovací seznam přepíná ukazatel; škála je vždy přepočítaná na jeho rozsah.

In [26]:
kmap = X.set_index("lau").reindex(LAUS)

def kov_hodnoty(c):
    if c == "ma_mamocentrum":
        return ["ano" if v else "ne" for v in kmap[c]]
    return [cz(v, 0 if abs(v) > 1000 else 1) for v in kmap[c]]

def kov_cdata(c):
    return np.c_[kmap.okres, kmap.kraj, kov_hodnoty(c),
                 [cz(v) for v in kmap.mamo_2y], [cz(v) for v in kmap.prev]]

def kov_htmpl(c):
    jm, jed = POPIS[c]
    jed = "" if c == "ma_mamocentrum" else f" {jed}"
    return (f"<b>%{{customdata[0]}}</b> · %{{customdata[1]}}<br>"
            f"<span style='color:{MUTED}'>{jm}</span><br><br>"
            f"Hodnota: <b>%{{customdata[2]}}{jed}</b><br><br>"
            "Mamograf (2 roky): %{customdata[3]} %<br>"
            "Preventivní prohlídka: %{customdata[4]} %<extra></extra>")

c0 = KOVARIATY[0]
kfig = go.Figure(go.Choropleth(
    geojson=GEO, locations=LAUS, z=kmap[c0],
    customdata=kov_cdata(c0), hovertemplate=kov_htmpl(c0),
    colorscale=BLUES, marker_line_color=SURFACE, marker_line_width=0.8,
    zmin=float(kmap[c0].min()), zmax=float(kmap[c0].max()),
    colorbar=skala(f"{POPIS[c0][0]}<br>[{POPIS[c0][1]}]"), showlegend=False))
kfig.add_trace(pracoviste())

kfig.update_layout(**layout("Socioekonomický profil okresů",
                            f"ČSÚ {ROK} a SLDB 2021 · rozbalovací seznam mění ukazatel"))
mapa_geo(kfig)
kfig.update_layout(
    height=600, margin=dict(l=10, r=10, t=100, b=20),
    showlegend=True, legend=LEGENDA_MAPA,
    updatemenus=[dict(type="dropdown", x=1.0, xanchor="right", y=1.13, yanchor="top",
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12), showactive=True,
                      buttons=[dict(label=POPIS[c][0], method="restyle", args=[{
                          "z": [kmap[c]], "customdata": [kov_cdata(c)],
                          "hovertemplate": [kov_htmpl(c)],
                          "zmin": [float(kmap[c].min())], "zmax": [float(kmap[c].max())],
                          "colorbar.title.text": [f"{POPIS[c][0]}<br>[{POPIS[c][1]}]"]},
                          [0]])                  # jen choropleta
                               for c in KOVARIATY])])
kfig.write_html(OUT / "mapa_kovariaty.html", include_plotlyjs="cdn")
kfig

### 8.2 Vysvětlují pokrytí?

Pearsonovo *r* mezi každým ukazatelem a pokrytím (průměr 2020–2024).
Testů je přes čtyřicet, proto k nim přidáváme **Benjamini–Hochbergovo *q***:
při čtyřiceti testech vyjdou dva „významné" výsledky čirou náhodou.

In [27]:
def bh(p):
    '''Benjamini–Hochberg: korekce na mnohonásobné testování.'''
    p = np.asarray(p, float)
    o = np.argsort(p)
    m = len(p)
    q = np.empty(m)
    q[o] = np.minimum.accumulate((p[o] * m / np.arange(1, m + 1))[::-1])[::-1]
    return np.minimum(q, 1)

rows = []
for c in KOVARIATY:
    g = X.dropna(subset=[c])
    rm, pm = stats.pearsonr(g[c], g.mamo_2y)
    rp, pp = stats.pearsonr(g[c], g.prev)
    rows.append({"ukazatel": POPIS[c][0], "kod": c, "n": len(g),
                 "r_mamograf": rm, "p_mamograf": pm,
                 "r_prevence": rp, "p_prevence": pp})
KORK = pd.DataFrame(rows)
KORK["q_mamograf"] = bh(KORK.p_mamograf)
KORK["q_prevence"] = bh(KORK.p_prevence)
KORK = KORK.reindex(KORK.r_mamograf.abs().sort_values().index)
KORK.to_csv(OUT / "korelace_kovariaty.csv", index=False)
KORK.sort_values("r_mamograf", key=abs, ascending=False).round(3).head(20)

,ukazatel,kod,n,r_mamograf,p_mamograf,r_prevence,p_prevence,q_mamograf,q_prevence
25,preventivní gynekologická prohlídka za rok,gyn_prevence_pct,77,0.463,0.000,0.144,0.211,0.001,0.443
31,test na okultní krvácení za rok,toks_pct,77,0.404,0.000,0.417,0.000,0.006,0.007
30,cytologie děložního čípku za rok,cytologie_pct,77,0.374,0.001,0.289,0.011,0.012,0.068
29,léčená rakovina prsu,rakovina_prs_na1000,77,0.297,0.009,0.101,0.382,0.081,0.601
24,mamografie mimo okres bydliště (měřeno),dojizdka_mamo_pct,77,-0.295,0.009,-0.323,0.004,0.081,0.054
41,volby 2025: SPD,volby_SPD_pct,77,-0.288,0.011,0.003,0.979,0.081,0.993
33,hypertenze (dolní odhad),hypertenze_pct,77,0.254,0.026,0.210,0.067,0.163,0.172
8,ženy s cizím občanstvím,cizinky_pct,77,-0.230,0.045,-0.085,0.464,0.245,0.685
22,okres má mamografické pracoviště,ma_mamocentrum,77,0.200,0.081,0.245,0.032,0.395,0.124
14,vdovy a rozvedené,vdovy_rozvedene_pct,77,-0.194,0.092,0.230,0.044,0.403,0.129


In [28]:
tor = go.Figure()
for col, barva, jmeno in [("r_mamograf", S1, "mamografický screening"),
                          ("r_prevence", S2, "preventivní prohlídky")]:
    q = KORK[col.replace("r_", "q_")]
    tor.add_trace(go.Bar(
        y=KORK.ukazatel, x=KORK[col], orientation="h", name=jmeno,
        marker=dict(color=barva, line=dict(color=SURFACE, width=2)),
        customdata=np.c_[KORK[col.replace("r_", "p_")], q],
        hovertemplate=("<b>%{y}</b><br>r = %{x:.3f}<br>p = %{customdata[0]:.3f}"
                       "<br>q (BH) = %{customdata[1]:.3f}<extra></extra>")))
nej_ = KORK.loc[KORK.r_mamograf.abs().idxmax()]
tor.update_layout(**layout(
    f"Po korekci obstojí u mamografie {int((KORK.q_mamograf < 0.05).sum())} z {len(KORK)} "
    f"ukazatelů · nejsilnější: {nej_.ukazatel} (r = {cz(nej_.r_mamograf, 2)})",
    "Pearsonovo r, pokrytí průměrované za 2020–2024 · 77 okresů · "
    "korekce na mnohonásobné testování podle Benjamini–Hochberga"))
tor.update_layout(height=max(560, 34 * len(KORK) + 190),
                  margin=dict(l=250, r=40, t=100, b=90),
                  barmode="group", bargap=0.24, bargroupgap=0.12,
                  xaxis=dict(title="Pearsonovo r", range=[-0.55, 0.55],
                             gridcolor=GRID, zeroline=True, zerolinecolor=AXIS,
                             zerolinewidth=1, tickfont=dict(color=MUTED)),
                  yaxis=dict(tickfont=dict(size=11.5, color=INK2), showgrid=False),
                  legend=dict(orientation="h", y=-0.10, yanchor="top", x=0))
tor.write_html(OUT / "kovariaty_korelace.html", include_plotlyjs="cdn")
tor

### 8.3 Pohled zblízka

In [29]:
ksc = go.Figure()
buttons = []
for i, c in enumerate(SPOJITE):
    g = X.dropna(subset=[c])
    r, pv = stats.pearsonr(g[c], g.mamo_2y)
    k = np.polyfit(g[c], g.mamo_2y, 1)
    xs = np.linspace(g[c].min(), g[c].max(), 2)
    for má, barva, jmeno in [(True, S1, "má vlastní pracoviště"),
                             (False, S2, "bez vlastního pracoviště")]:
        gg = g[g.vlastni_pracoviste == má]
        ksc.add_trace(go.Scatter(
            x=gg[c], y=gg.mamo_2y, mode="markers", name=jmeno, visible=(i == 0),
            legendgroup=jmeno, showlegend=(i == 0),
            marker=dict(size=9, color=barva, line=dict(color=SURFACE, width=2), opacity=0.9),
            customdata=np.c_[gg.okres, gg.kraj],
            hovertemplate=("<b>%{customdata[0]}</b> · %{customdata[1]}<br>"
                           "%{x:.1f}<br>pokrytí: %{y:.1f} %<extra></extra>")))
    ksc.add_trace(go.Scatter(x=xs, y=np.polyval(k, xs), mode="lines", visible=(i == 0),
                             name="lineární proložení", legendgroup="fit",
                             showlegend=(i == 0), line=dict(color=MUTED, width=2),
                             hoverinfo="skip"))
    buttons.append(dict(label=POPIS[c][0], method="update", args=[
        {"visible": [j // 3 == i for j in range(3 * len(SPOJITE))]},
        {"title.text": (f"<b>{POPIS[c][0]} vs. mamografický screening</b>"
                        f'<br><span style="font-size:12px;color:{INK2}">'
                        f"Pearson r = {r:.2f} (p = {pv:.3f}) · 77 okresů · "
                        f"pokrytí 2020–2024</span>"),
         "xaxis.title.text": f"{POPIS[c][0]} [{POPIS[c][1]}]"}]))

c0 = SPOJITE[0]
g0 = X.dropna(subset=[c0])
r0, p0 = stats.pearsonr(g0[c0], g0.mamo_2y)
ksc.update_layout(**layout(f"{POPIS[c0][0]} vs. mamografický screening",
                           f"Pearson r = {r0:.2f} (p = {p0:.3f}) · 77 okresů · "
                           f"pokrytí 2020–2024"))
ksc.update_layout(
    height=580, margin=dict(l=60, r=30, t=100, b=130),
    legend=dict(orientation="h", y=-0.20, yanchor="top", x=0),
    xaxis_title=f"{POPIS[c0][0]} [{POPIS[c0][1]}]",
    yaxis_title="mamografický screening [% za 2 roky]",
    updatemenus=[dict(type="dropdown", x=1.0, xanchor="right", y=1.16, yanchor="top",
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12), showactive=True, buttons=buttons)])
ksc.write_html(OUT / "kovariaty_scatter.html", include_plotlyjs="cdn")
ksc

### 8.4 Vícerozměrný model a rozklad variance

Nakonec dvě otázky: vysvětlí kovariáty pokrytí **dohromady**, a kolik rozdílů
mezi okresy padá na vrub **kraji** (tedy organizaci péče, ne složení obyvatel)?

In [30]:
def ols(y, Xm, nazvy):
    '''OLS se standardizovanými prediktory; beta = změna na 1 směr. odchylku.'''
    Z = np.c_[np.ones(len(Xm)), (Xm - Xm.mean(0)) / Xm.std(0)]
    beta, *_ = np.linalg.lstsq(Z, y, rcond=None)
    res = y - Z @ beta
    dfree = len(y) - Z.shape[1]
    se = np.sqrt(np.diag((res @ res / dfree) * np.linalg.pinv(Z.T @ Z)))
    t = beta / se
    r2 = 1 - res.var() / y.var()
    r2adj = 1 - (1 - r2) * (len(y) - 1) / dfree
    tab = pd.DataFrame({"prediktor": ["(konstanta)"] + nazvy, "beta": beta, "t": t,
                        "p": 2 * (1 - stats.t.cdf(abs(t), dfree))})
    return tab, r2, r2adj

MODEL = ["vs_zeny_pct", "nezam_zeny_pct", "prisp_bydleni_Kc_obyv",
         "invalid_duchod_zeny_pct", "prumerny_vek_zeny",
         "cizinky_pct", "vdovy_rozvedene_pct", "obce_0_pct", "obce_4_pct",
         "volby_ANO_pct", "dojizdka_mamo_pct", "gyn_prevence_pct",
         # zkušebně všechny ukazatele z diagnóz (kap. 8.0), k pozdější probírce
         "diag_prs_na100", "nezhoubne_prs_na1000", "rakovina_prs_na1000",
         "cytologie_pct", "toks_pct", "diabetes_pct", "hypertenze_pct",
         "chopn_pct", "deprese_pct", "obezita_pct"]
# „okres má pracoviště“ v modelu není: měřená dojížďka ho obsahuje celý
# (bez pracoviště = 100 % mimo okres, r = −0,81) a nese informaci navíc
MODEL = [c for c in MODEL if c in X.columns]
g = X.dropna(subset=MODEL + ["mamo_2y", "prev"])
for cil, popis in [("mamo_2y", "mamografický screening"),
                   ("prev", "preventivní prohlídky")]:
    tab, r2, r2a = ols(g[cil].values, g[MODEL].values, [POPIS[c][0] for c in MODEL])
    print(f"\n=== {popis}: R² = {r2:.3f}, adj. R² = {r2a:.3f} (n = {len(g)}) ===")
    print(tab.round(3).to_string(index=False))

print("\n=== rozklad variance mezi okresy ===")
for cil, popis in [("mamo_2y", "mamografický screening"),
                   ("prev", "preventivní prohlídky")]:
    gg = X.dropna(subset=[cil])
    prumer = gg[cil].mean()
    ss_tot = ((gg[cil] - prumer) ** 2).sum()
    agg = gg.groupby("kraj")[cil].agg(["mean", "count"])
    ss_kraj = ((agg["mean"] - prumer) ** 2 * agg["count"]).sum()
    print(f"  {popis:<24} mezi kraji {ss_kraj/ss_tot:6.1%} · uvnitř krajů "
          f"{1 - ss_kraj/ss_tot:6.1%}")


=== mamografický screening: R² = 0.658, adj. R² = 0.519 (n = 77) ===
                                 prediktor   beta       t     p
                               (konstanta) 53.398 151.877 0.000
                  vysokoškolačky, ženy 15+ -0.146  -0.151 0.881
                  podíl nezaměstnaných žen -1.526  -1.965 0.055
         příspěvek na bydlení na obyvatele -0.723  -0.782 0.438
            příjemkyně invalidního důchodu  0.301   0.652 0.517
                          průměrný věk žen -2.380  -3.147 0.003
                   ženy s cizím občanstvím -1.112  -1.904 0.062
                         vdovy a rozvedené  0.486   0.479 0.634
               obyvatelé obcí do 499 obyv.  0.982   1.872 0.067
              obyvatelé obcí 50 000+ obyv.  1.745   2.349 0.022
                           volby 2025: ANO -0.086  -0.097 0.923
   mamografie mimo okres bydliště (měřeno) -0.526  -1.114 0.270
preventivní gynekologická prohlídka za rok  0.686   1.182 0.242
               diagnostické zobraz

### 8.5 Vážení počtem žen

Dosud měl každý okres stejnou váhu — Jeseník s 9 tisíci ženami 45+ stejnou jako
Praha s 351 tisíci. To odpovídá otázce *„liší se okresy?"*. Otázce *„jak je na
tom průměrná žena?"* odpovídá vážení počtem žen 45+ v okrese; velké okresy pak
táhnou výsledek víc.

Obojí je legitimní a každé měří něco jiného. Rozdíl mezi nimi je sám o sobě
informace: když vážením korelace spadne, drží ji malé okresy; když vzroste,
drží ji velká města.

Vážená Pearsonova korelace se počítá přes vážené momenty, hladina významnosti
z **Kishovy efektivní velikosti vzorku** $n_{ef} = (\sum w)^2 / \sum w^2$ —
u 77 okresů s velmi nerovnými váhami vychází výrazně nižší než 77, takže
vážené testy jsou konzervativnější.

In [31]:
def wcorr(x, y, w):
    '''Vážená Pearsonova korelace + p podle Kishovy efektivní velikosti vzorku.'''
    x, y, w = np.asarray(x, float), np.asarray(y, float), np.asarray(w, float)
    ok = np.isfinite(x) & np.isfinite(y) & np.isfinite(w)
    x, y, w = x[ok], y[ok], w[ok]
    p = w / w.sum()
    mx, my = (p * x).sum(), (p * y).sum()
    cov = (p * (x - mx) * (y - my)).sum()
    r = cov / np.sqrt((p * (x - mx) ** 2).sum() * (p * (y - my) ** 2).sum())
    n_ef = w.sum() ** 2 / (w ** 2).sum()          # Kish
    t = r * np.sqrt(max(n_ef - 2, 1) / max(1 - r ** 2, 1e-12))
    return r, 2 * (1 - stats.t.cdf(abs(t), max(n_ef - 2, 1))), n_ef

w_all = X.zeny.values
podil = (X.set_index("okres").zeny / w_all.sum()).sort_values(ascending=False)
print(f"vážení: ženy 45+ v okrese, {cz(w_all.sum(), 0)} celkem")
print(f"efektivní velikost vzorku (Kish): "
      f"{w_all.sum()**2 / (w_all**2).sum():.1f} místo 77 okresů")
print(f"tři největší okresy nesou {100 * podil.head(3).sum():.0f} % váhy: "
      + ", ".join(f"{k} {100*v:.1f} %" for k, v in podil.head(3).items()))

vážení: ženy 45+ v okrese, 2 813 434 celkem
efektivní velikost vzorku (Kish): 37.4 místo 77 okresů
tři největší okresy nesou 19 % váhy: Praha 11.9 %, Brno-město 3.6 %, Ostrava-město 3.0 %


In [32]:
# --- a) hlavní vztah prevence × mamograf, po věkových pásmech ---
rows = []
for band in BAND_ORDER:
    g = d[d.band == band].dropna(subset=["prev", "mamo_2y"])
    r0, p0 = stats.pearsonr(g.prev, g.mamo_2y)
    rw, pw, nef = wcorr(g.prev, g.mamo_2y, g.zeny)
    rows.append({"pásmo": band, "r": r0, "p": p0,
                 "r vážené": rw, "p vážené": pw, "n_ef": nef})
KOR_W = pd.DataFrame(rows)
KOR_W.to_csv(OUT / "korelace_pasma_vazene.csv", index=False)
print("Prevence × mamograf — nevážené vs. vážené počtem žen (rok 2024)")
KOR_W.round(3)

Prevence × mamograf — nevážené vs. vážené počtem žen (rok 2024)


,pásmo,r,p,r vážené,p vážené,n_ef
0,45+ celkem,0.121,0.295,0.113,0.502,37.447
1,45–49,0.092,0.424,0.094,0.599,33.511
2,50–54,0.165,0.152,0.175,0.296,37.512
3,55–59,0.131,0.258,0.115,0.490,38.292
4,60–64,0.074,0.523,0.083,0.615,39.334
5,65–69,0.100,0.387,0.083,0.604,41.165
6,70–74,0.106,0.358,0.070,0.667,39.792
7,75–79,0.183,0.112,0.198,0.244,36.343
8,80–84,0.223,0.051,0.328,0.051,35.865
9,85+,0.210,0.067,0.310,0.075,33.907


In [33]:
# --- b) kovariáty, vážené vs. nevážené ---
rows = []
for c in KOVARIATY:
    g = X.dropna(subset=[c])
    r0, p0 = stats.pearsonr(g[c], g.mamo_2y)
    rw, pw, _ = wcorr(g[c], g.mamo_2y, g.zeny)
    rp0, _ = stats.pearsonr(g[c], g.prev)
    rpw, _, _ = wcorr(g[c], g.prev, g.zeny)
    rows.append({"ukazatel": POPIS[c][0], "kod": c,
                 "r_mamograf": r0, "r_mamograf_vazene": rw,
                 "p_mamograf_vazene": pw, "rozdil": rw - r0,
                 "r_prevence": rp0, "r_prevence_vazene": rpw})
KOVW = pd.DataFrame(rows)
KOVW["q_mamograf_vazene"] = bh(KOVW.p_mamograf_vazene)
KOVW = KOVW.reindex(KOVW.r_mamograf_vazene.abs().sort_values().index)
KOVW.to_csv(OUT / "korelace_kovariaty_vazene.csv", index=False)
KOVW.sort_values("r_mamograf_vazene", key=abs, ascending=False)[
    ["ukazatel", "r_mamograf", "r_mamograf_vazene", "p_mamograf_vazene",
     "q_mamograf_vazene", "rozdil"]].round(3).head(15)

,ukazatel,r_mamograf,r_mamograf_vazene,p_mamograf_vazene,q_mamograf_vazene,rozdil
25,preventivní gynekologická prohlídka za rok,0.463,0.487,0.002,0.092,0.024
31,test na okultní krvácení za rok,0.404,0.432,0.007,0.158,0.028
30,cytologie děložního čípku za rok,0.374,0.396,0.015,0.163,0.023
8,ženy s cizím občanstvím,-0.230,-0.395,0.015,0.163,-0.166
11,hustota zalidnění,-0.124,-0.363,0.026,0.232,-0.238
33,hypertenze (dolní odhad),0.254,0.324,0.049,0.308,0.070
17,obyvatelé obcí do 499 obyv.,0.178,0.318,0.054,0.308,0.140
3,ženy mimo pracovní sílu,0.074,0.307,0.063,0.308,0.233
10,kupní cena domů,-0.036,-0.307,0.063,0.308,-0.271
18,obyvatelé obcí 500–1 999 obyv.,0.061,0.287,0.083,0.364,0.226


In [34]:
dmb = go.Figure()
for i, r_ in enumerate(KOVW.itertuples()):
    dmb.add_trace(go.Scatter(
        x=[r_.r_mamograf, r_.r_mamograf_vazene], y=[r_.ukazatel] * 2,
        mode="lines", line=dict(color=GRID, width=2),
        hoverinfo="skip", showlegend=False))
dmb.add_trace(go.Scatter(
    x=KOVW.r_mamograf, y=KOVW.ukazatel, mode="markers", name="každý okres stejně",
    marker=dict(size=9, color=S1, line=dict(color=SURFACE, width=2)),
    hovertemplate="<b>%{y}</b><br>r = %{x:.3f}<extra>nevážené</extra>"))
dmb.add_trace(go.Scatter(
    x=KOVW.r_mamograf_vazene, y=KOVW.ukazatel, mode="markers",
    name="váženo počtem žen 45+",
    marker=dict(size=9, color=S2, line=dict(color=SURFACE, width=2)),
    customdata=np.c_[KOVW.p_mamograf_vazene, KOVW.q_mamograf_vazene],
    hovertemplate=("<b>%{y}</b><br>r = %{x:.3f}<br>p = %{customdata[0]:.3f}"
                   "<br>q (BH) = %{customdata[1]:.3f}<extra>vážené</extra>")))
posun = (KOVW.r_mamograf_vazene - KOVW.r_mamograf).abs()
dmb.update_layout(**layout(
    "Jak se korelace posunou po vážení počtem žen",
    f"Pearsonovo r vůči mamografickému pokrytí · 77 okresů · "
    f"u {(posun > 0.15).sum()} z {len(KOVW)} ukazatelů se r posune o víc než 0,15, "
    f"ale po korekci není významný ani jeden (min. q = {KOVW.q_mamograf_vazene.min():.2f})"))
dmb.update_layout(height=max(560, 30 * len(KOVW) + 190),
                  margin=dict(l=250, r=40, t=100, b=90),
                  xaxis=dict(title="Pearsonovo r", range=[-0.45, 0.45],
                             gridcolor=GRID, zeroline=True, zerolinecolor=AXIS,
                             zerolinewidth=1, tickfont=dict(color=MUTED)),
                  yaxis=dict(tickfont=dict(size=11.5, color=INK2), showgrid=False),
                  legend=dict(orientation="h", y=-0.09, yanchor="top", x=0))
dmb.write_html(OUT / "kovariaty_vazene.html", include_plotlyjs="cdn")
dmb

Body vlevo (modré) jsou korelace, kde má každý okres váhu 1; body vpravo
(oranžové) tytéž korelace vážené počtem žen 45+. Delší spojnice = ukazatel,
jehož vztah k pokrytí drží hlavně velká města, nebo naopak hlavně malé okresy.

In [35]:
# --- c) vážený model (WLS) a vážené průměry ---
def wls(y, Xm, w, nazvy):
    '''OLS na řádcích přenásobených odmocninou váhy = vážená regrese.'''
    Z = np.c_[np.ones(len(Xm)), (Xm - Xm.mean(0)) / Xm.std(0)]
    sw = np.sqrt(w / w.mean())[:, None]
    Zw, yw = Z * sw, y * sw[:, 0]
    beta, *_ = np.linalg.lstsq(Zw, yw, rcond=None)
    res_w = yw - Zw @ beta
    dfree = len(y) - Z.shape[1]
    se = np.sqrt(np.diag((res_w @ res_w / dfree) * np.linalg.pinv(Zw.T @ Zw)))
    t = beta / se
    # R² se počítá v původním měřítku proti VÁŽENÉMU průměru — jinak by vyšlo
    # nesmyslně vysoko, protože baseline by byl průměr přeškálovaných hodnot
    res = y - Z @ beta
    ybar_w = np.average(y, weights=w)
    r2 = 1 - (w * res ** 2).sum() / (w * (y - ybar_w) ** 2).sum()
    r2adj = 1 - (1 - r2) * (len(y) - 1) / dfree
    return pd.DataFrame({"prediktor": ["(konstanta)"] + nazvy, "beta": beta, "t": t,
                         "p": 2 * (1 - stats.t.cdf(abs(t), dfree))}), r2, r2adj

g = X.dropna(subset=MODEL + ["mamo_2y", "prev"])
for cil, nazev in [("mamo_2y", "mamografický screening"),
                   ("prev", "preventivní prohlídky")]:
    tab, r2, r2a = wls(g[cil].values, g[MODEL].values, g.zeny.values,
                       [POPIS[c][0] for c in MODEL])
    print(f"\n=== VÁŽENĚ — {nazev}: R² = {r2:.3f}, adj. R² = {r2a:.3f} "
          f"(n = {len(g)}) ===")
    print(tab.round(3).to_string(index=False))

print("\n=== průměrné pokrytí: prostý průměr okresů vs. vážený ===")
for cil, nazev in [("mamo_2y", "mamografický screening"),
                   ("prev", "preventivní prohlídky")]:
    gg = X.dropna(subset=[cil])
    prosty = gg[cil].mean()
    vazeny = np.average(gg[cil], weights=gg.zeny)
    print(f"  {nazev:<24} okresní průměr {prosty:5.1f} % · "
          f"vážený {vazeny:5.1f} % · rozdíl {vazeny - prosty:+.1f} p. b.")


=== VÁŽENĚ — mamografický screening: R² = 0.665, adj. R² = 0.529 (n = 77) ===
                                 prediktor   beta       t     p
                               (konstanta) 53.379 143.272 0.000
                  vysokoškolačky, ženy 15+ -0.105  -0.108 0.915
                  podíl nezaměstnaných žen -0.984  -1.267 0.211
         příspěvek na bydlení na obyvatele -1.345  -1.582 0.120
            příjemkyně invalidního důchodu  0.259   0.513 0.610
                          průměrný věk žen -2.725  -3.528 0.001
                   ženy s cizím občanstvím -1.631  -2.909 0.005
                         vdovy a rozvedené  1.168   1.097 0.277
               obyvatelé obcí do 499 obyv.  1.047   1.976 0.053
              obyvatelé obcí 50 000+ obyv.  2.007   2.779 0.007
                           volby 2025: ANO -0.405  -0.434 0.666
   mamografie mimo okres bydliště (měřeno) -0.330  -0.656 0.515
preventivní gynekologická prohlídka za rok  0.574   0.934 0.355
               diagnostic

**Jak to číst.**

* **Jednotlivě obstojí po korekci tři ukazatele a všechny měří totéž: jestli
  ženy chodí na prevenci.** Preventivní gynekologická prohlídka (r = 0,46,
  q = 0,001), test na okultní krvácení (r = 0,40, q = 0,006) a cytologie děložního
  čípku (r = 0,37, q = 0,012). Kde ženy chodí na jedno preventivní vyšetření,
  chodí i na ostatní, včetně mamografu. Gynekologie a cytologie spolu souvisejí
  (r = 0,59), protože obojí se dělá při téže návštěvě.
* **Diagnostická péče o prs screening nenahrazuje.** Kdyby ženy chodily na
  mamograf „diagnostickou cestou“ místo screeningu, mělo by diagnostické zobrazení
  prsu s pokrytím souviset záporně. Vychází slabě kladně (r = 0,18) a v modelu
  nulově.
* **Rakovina prsu vychází kladně (r = 0,30), ale to je obrácená příčinnost.**
  Kde se víc screenuje, tam se víc nádorů najde a léčí. Není to důvod, proč ženy
  na screening chodí. Ostatní nemocnost (diabetes, CHOPN, deprese, obezita)
  s pokrytím nesouvisí; hypertenze slabě kladně (r = 0,25), nejspíš jako
  ukazatel toho, jak často lidé v okrese chodí k lékaři.
* **Model má 22 prediktorů na 77 okresů, je tedy přeučený.** Adj. R² = 0,52 (bez
  diagnóz 0,34), ale jednotlivé koeficienty jsou nestabilní. Průkazné jsou:
  * **léčená rakovina prsu** (β = +1,4 p. b. na směrodatnou odchylku, p = 0,001),
    viz obrácená příčinnost výše;
  * **průměrný věk žen** (β = −2,4, p = 0,003);
  * **test na okultní krvácení** (β = +1,3, p = 0,021);
  * **podíl obyvatel obcí nad 50 000** (β = +1,7, p = 0,022).

  Gynekologie v modelu průkazná není (β = +0,7, p = 0,24). Dělí se o efekt
  s cytologií a testy, které měří stejné chování. Těsně pod hranicí (p 0,05–0,07)
  jsou nezaměstnanost žen, cizinky, cytologie, nezhoubné nálezy prsu, malé obce
  a CHOPN. **Než z modelu cokoli vyvodíme, je potřeba ho probrat:** ze tří
  ukazatelů preventivního chování nechat jeden, rakovinu prsu vyřadit kvůli
  obrácené příčinnosti a nemocnost nechat jen tam, kde něco přidá.
* **Preventivní prohlídky u praktika** vysvětluje model hůř (adj. R² 0,35).
  Nejsilnější je test na okultní krvácení, který se dělá právě při prohlídce
  u praktika, takže měří zčásti totéž.
* **Pozor u gynekologie a cytologie na společný jmenovatel.** Obojí i mamografii
  dělíme ženami s bydlištěm v okrese podle ČSÚ. Kde je v okrese hodně
  nepojištěných žen, sníží to všechny tři ukazatele najednou. Podíl cizinek je
  proto v modelu.
* Zhruba **pětina rozdílů v mamografickém pokrytí leží mezi kraji**. To ukazuje
  spíš na organizaci péče (zvací systém pojišťoven, kapacita pracovišť, praxe
  gynekologů) než na složení obyvatelstva.
* **Vážení počtem žen** (kap. 8.5) korelace rozhýbe: u podílu cizinek z −0,23
  na −0,40, u hustoty zalidnění z −0,12 na −0,36. Tři preventivní ukazatele drží
  (gynekologie 0,46 → 0,49), korekci ale po vážení nepřežije nic: efektivní
  velikost vzorku klesne ze 77 na 37 (samotná Praha nese 12 % váhy). Vážený model
  vychází podobně jako nevážený (adj. R² 0,53).
* Všechny vztahy v této kapitole jsou **ekologické**: počítají se přes okresy,
  ne přes jednotlivé ženy. Z toho, jak se chová okres, nelze usuzovat na
  chování konkrétní ženy (ekologický klam). To platí i pro volební ukazatele.

### 8.6 Model po věkových pásmech

Stejný model jako v 8.4 (22 prediktorů, pokrytí průměrované za 2020–2024),
natrénovaný zvlášť pro každé pětileté pásmo. Cílovou proměnnou standardizujeme,
takže **beta = o kolik směrodatných odchylek se změní pokrytí, když prediktor
vzroste o jednu směrodatnou odchylku**. Bez toho by koeficienty u pásem s nízkým
pokrytím (80+) vycházely malé jen kvůli měřítku a pásma by nešla porovnat.

Modelů je deset na metriku, tedy 220 koeficientů. Hvězdička značí *p* < 0,05,
dvě hvězdičky průkaznost i po Benjamini–Hochbergově korekci přes všech 220
koeficientů dané metriky. Pětiletá pásma mají v malých okresech jen stovky žen,
takže odhady jsou zašuměnější než u 45+ celkem.

In [36]:
POKR_B = (D[D.rok.between(ROK - 4, ROK)]
          .groupby(["band", "lau"], observed=True, as_index=False)[["mamo_2y", "prev"]].mean())
CILE = [("mamo_2y", "mamografický screening"), ("prev", "preventivní prohlídky")]

koef, fit = [], []
for band in BAND_ORDER:
    gb = (POKR_B[POKR_B.band == band].merge(X[["lau"] + MODEL], on="lau")
          .dropna(subset=MODEL + ["mamo_2y", "prev"]))
    for cil, _ in CILE:
        y = gb[cil].values
        tab, r2, r2a = ols((y - y.mean()) / y.std(), gb[MODEL].values, MODEL)
        koef.append(tab.iloc[1:].assign(band=band, cil=cil))       # bez konstanty
        fit.append({"band": band, "cil": cil, "n": len(gb), "R2": r2, "R2_adj": r2a})
KOEF = pd.concat(koef, ignore_index=True)
FIT = pd.DataFrame(fit)
KOEF["q"] = KOEF.groupby("cil").p.transform(bh)
KOEF.to_csv(OUT / "model_po_pasmech.csv", index=False)

for cil, nazev in CILE:
    print(f"\n=== {nazev}: průkazné prediktory (p < 0,05; ** = i po BH) ===")
    for band in BAND_ORDER:
        k = KOEF[(KOEF.cil == cil) & (KOEF.band == band) & (KOEF.p < 0.05)]
        f_ = FIT[(FIT.cil == cil) & (FIT.band == band)].iloc[0]
        sig = ", ".join(f"{POPIS[r.prediktor][0]} {r.beta:+.2f}{'**' if r.q < 0.05 else ''}"
                        for r in k.sort_values("beta", key=abs, ascending=False).itertuples())
        print(f"  {band:<11} adj. R² {f_.R2_adj:5.2f} │ {sig or '–'}")


=== mamografický screening: průkazné prediktory (p < 0,05; ** = i po BH) ===
  45+ celkem  adj. R²  0.52 │ průměrný věk žen -0.54, obyvatelé obcí 50 000+ obyv. +0.40, léčená rakovina prsu +0.32**, test na okultní krvácení za rok +0.29
  45–49       adj. R²  0.56 │ podíl nezaměstnaných žen -0.35, průměrný věk žen -0.35, ženy s cizím občanstvím -0.34, obyvatelé obcí do 499 obyv. +0.31, léčená rakovina prsu +0.28, test na okultní krvácení za rok +0.25
  50–54       adj. R²  0.59 │ ženy s cizím občanstvím -0.46**, průměrný věk žen -0.45, podíl nezaměstnaných žen -0.39, test na okultní krvácení za rok +0.29, léčená rakovina prsu +0.28, nezhoubné nálezy prsu -0.24
  55–59       adj. R²  0.59 │ obyvatelé obcí 50 000+ obyv. +0.38, podíl nezaměstnaných žen -0.36, ženy s cizím občanstvím -0.36, průměrný věk žen -0.32, léčená rakovina prsu +0.30**, test na okultní krvácení za rok +0.29, obyvatelé obcí do 499 obyv. +0.25, nezhoubné nálezy prsu -0.21
  60–64       adj. R²  0.54 │ podíl nezaměstnan

In [37]:
def mb_matice(cil):
    k = KOEF[KOEF.cil == cil].pivot(index="prediktor", columns="band", values="beta")
    p = KOEF[KOEF.cil == cil].pivot(index="prediktor", columns="band", values="p")
    q = KOEF[KOEF.cil == cil].pivot(index="prediktor", columns="band", values="q")
    k, p, q = (t.reindex(index=MODEL, columns=BAND_ORDER) for t in (k, p, q))
    txt = [[f"{cz(k.iat[a, b], 2)}{'**' if q.iat[a, b] < 0.05 else '*' if p.iat[a, b] < 0.05 else ''}"
            for b in range(k.shape[1])] for a in range(k.shape[0])]
    hov = [[(f"<b>{POPIS[MODEL[a]][0]}</b> · {BAND_ORDER[b]}<br>"
             f"beta = {cz(k.iat[a, b], 2)} SD<br>p = {cz(p.iat[a, b], 3)}"
             f"<br>q (BH) = {cz(q.iat[a, b], 3)}") for b in range(k.shape[1])]
           for a in range(k.shape[0])]
    r2 = FIT[FIT.cil == cil].set_index("band").reindex(BAND_ORDER).R2_adj
    osa = [f"<b>{b}</b><br><span style='color:{MUTED}'>R² {cz(v, 2)}</span>"
           for b, v in zip(BAND_ORDER, r2)]
    return k.values, txt, hov, osa

def mb_nadpis(nazev):
    return (f"<b>Co předpovídá pokrytí v jednotlivých věkových pásmech — {nazev}</b>"
            f'<br><span style="font-size:12px;color:{INK2}">standardizované beta z modelu '
            f"s {len(MODEL)} prediktory · * p < 0,05 · ** i po korekci BH · pod pásmem adj. R²</span>")

zlim = float(np.ceil(KOEF.beta.abs().max() * 10) / 10)
mm = {cil: mb_matice(cil) for cil, _ in CILE}
z0, t0, h0, o0 = mm["mamo_2y"]
mb = go.Figure(go.Heatmap(
    z=z0, x=list(range(len(BAND_ORDER))), y=[POPIS[c][0] for c in MODEL],
    text=t0, texttemplate="%{text}", textfont=dict(size=11),
    customdata=h0, hovertemplate="%{customdata}<extra></extra>",
    colorscale=DIV, zmin=-zlim, zmax=zlim, xgap=2, ygap=2,
    colorbar=dict(title=dict(text="beta [SD]", side="top", font=dict(size=11, color=INK2)),
                  thickness=12, len=0.6, outlinewidth=0,
                  tickfont=dict(size=11, color=MUTED))))
mb.update_layout(**layout("", ""))
mb.update_layout(
    title=dict(text=mb_nadpis(CILE[0][1]), x=0.01, xanchor="left", font=dict(size=17)),
    height=max(660, 30 * len(MODEL) + 230), margin=dict(l=260, r=40, t=140, b=70),
    xaxis=dict(tickvals=list(range(len(BAND_ORDER))), ticktext=o0, side="top",
               showgrid=False, ticks="", linecolor=SURFACE, tickfont=dict(size=11.5)),
    yaxis=dict(autorange="reversed", showgrid=False, ticks="", linecolor=SURFACE,
               tickfont=dict(size=11.5, color=INK2)),
    updatemenus=[dict(type="buttons", direction="right", x=1.0, xanchor="right",
                      y=-0.04, yanchor="top", showactive=True, bgcolor=SURFACE,
                      bordercolor=AXIS, borderwidth=1, font=dict(size=12),
                      buttons=[dict(label=nazev, method="update", args=[
                          {"z": [mm[cil][0]], "text": [mm[cil][1]], "customdata": [mm[cil][2]]},
                          {"xaxis.ticktext": mm[cil][3], "title.text": mb_nadpis(nazev)}])
                               for cil, nazev in CILE])])
mb.write_html(OUT / "model_po_pasmech.html", include_plotlyjs="cdn")
mb

**Jak to číst.**

Model je teď přeučený (22 prediktorů na 77 okresů, viz 8.4), takže tabulka slouží
hlavně k výběru prediktorů, ne k závěrům.

* **Test na okultní krvácení** vychází kladně ve všech pásmech 45–79 let
  (beta +0,25 až +0,30), ale korekci nepřežije nikde. Preventivní chování drží
  napříč věkem, jen se v přeplněném modelu dělí mezi tři ukazatele
  (gynekologie, cytologie, test).
* **Léčená rakovina prsu** vychází kladně ve všech pásmech (+0,25 až +0,32)
  a v některých projde i korekcí. Je to ale obrácená příčinnost (screening nádory
  najde), ne vysvětlení pokrytí.
* **Průměrný věk žen** je záporný skoro všude a u 80+ projde korekcí (−0,57
  a −0,62). **Cizinky** zůstávají záporné v pásmech 45–59 let.
* **Velká města a nezaměstnanost** se po přidání diagnóz objevily nově: podíl
  obyvatel obcí nad 50 000 je kladný skoro ve všech pásmech (+0,28 až +0,50),
  nezaměstnanost žen záporná v pásmech 45–69 let (−0,35 až −0,39). Obojí jen
  bez korekce a obojí může být důsledek přeplněného modelu.
* **Dojížďka mimo okres** vychází průkazně (bez korekce) jen od 75 let (beta −0,24
  až −0,29). V mladších pásmech ji přebíjejí ukazatele preventivního chování.
* **Preventivní prohlídky u praktika** vysvětluje model lépe než dřív (adj. R²
  0,15–0,41). Nejsilnější je test na okultní krvácení, průkazný po korekci ve
  všech pásmech 45–79 let (beta +0,45 až +0,54), protože se dělá právě při
  prohlídce u praktika.

## 9 · Očkování proti chřipce a covidu

Chodí ženy na mamograf víc tam, kde se lidé víc očkují? Očkování je jiný druh
preventivního chování než prohlídka u praktika: člověk se pro ně musí rozhodnout
sám, podobně jako pro screening.

| Ukazatel | Zdroj | Čitatel / jmenovatel |
|---|---|---|
| chřipka před covidem | ÚZIS NR-28-02 | průměr proočkovanosti v sezónách 2017/18–2019/20 |
| chřipka po covidu | ÚZIS NR-28-02 | průměr proočkovanosti v sezónách 2022/23–2024/25 |
| změna chřipky | – | po − před, v procentních bodech |
| covid, 1. dávka | MZ ČR, `ockovani-zakladni-prehled` | ženy 45+ s 1. dávkou / ženy 45+ v okrese (ČSÚ 2021) |
| covid, 3. dávka | totéž | ženy 45+ s 3. dávkou (první booster) / ženy 45+ |

U chřipky bereme dvě populace: **65+** (cílová skupina hrazeného očkování,
věkově nejblíž screeningu) a **všechny věky**. Sezóna trvá od září do září, takže
2019/20 je ještě předcovidová (očkuje se na podzim). Sezóny 2020/21 a 2021/22
vynecháváme, protože v nich zájem o očkování proti chřipce krátkodobě vyskočil.

> **Pozor na dva zlomy v datech.**
> * Od sezóny 2023/24 ÚZIS k hrazeným očkováním přidává i **nehrazená z e-vakcinace
>   (ISIN)**. Část nárůstu „po covidu“ je tedy změna zdroje, ne chování.
> * Covidová data jsou podle **ORP bydliště**. Na okresy je skládáme přes RÚIAN
>   (každé ORP leží celé v jednom okrese). **Praha** v nich jako ORP není: bydliště
>   v Praze spadá do kategorie „nezařazení“ spolu s lidmi s neznámým bydlištěm.
>   Praha proto v covidových ukazatelích chybí (76 okresů).

In [38]:
PRED_COVID = ["2017-2018", "2018-2019", "2019-2020"]
PO_COVIDU  = ["2022-2023", "2023-2024", "2024-2025"]

def chripka(list_):
    '''Proočkovanost proti chřipce [%] po okresech (řádky) a sezónách (sloupce).

    Hlavička je dvouřádková: název sezóny stojí jen nad první ze tří buněk
    (demografie · počet vakcinovaných · proočkovanost), proto ffill.'''
    raw = pd.read_excel(F_CHRIPKA, sheet_name=list_, header=None)
    h = raw.index[raw[0] == "územní celek"][0]
    sezona = raw.iloc[h].ffill()
    sl = [j for j in raw.columns if raw.iloc[h + 1, j] == "proočkovanost vakcinovaných (%)"]
    t = raw.iloc[h + 2:, [0] + sl]
    t.columns = ["uzemi"] + [sezona[j].replace("sezóna ", "") for j in sl]
    t["lau"] = t.uzemi.replace({"Hl. m. Praha": "Praha"}).map(NA_LAU)
    t = t.dropna(subset=["lau"]).set_index("lau").drop(columns="uzemi")
    assert len(t) == 77, f"{list_}: spárováno {len(t)} okresů"
    return 100 * t.astype(float)

OCK = pd.DataFrame(index=LAUS)
for list_, kl in [("Chřipka_65", "chripka65"), ("Chřipka", "chripka")]:
    t = chripka(list_)
    OCK[f"{kl}_pred"]  = t[PRED_COVID].mean(axis=1)
    OCK[f"{kl}_po"]    = t[PO_COVIDU].mean(axis=1)
    OCK[f"{kl}_zmena"] = OCK[f"{kl}_po"] - OCK[f"{kl}_pred"]

cr65 = chripka("Chřipka_65").median()
print("medián okresní proočkovanosti 65+ po sezónách [%]:")
print(cr65.round(1).to_string())

medián okresní proočkovanosti 65+ po sezónách [%]:
2010-2011    14.7
2011-2012    15.4
2012-2013    15.4
2013-2014    17.2
2014-2015    17.0
2015-2016    17.5
2016-2017    18.8
2017-2018    19.3
2018-2019    20.5
2019-2020    22.3
2020-2021    23.1
2021-2022    24.0
2022-2023    23.4
2023-2024    25.0
2024-2025    24.1
2025-2026    24.1


In [39]:
# --- ORP -> okres (RÚIAN): ORP nese kód okresu, okres nese NUTS/LAU ---
f = CACHE / "ruian_orp_okresy.csv"
if f.exists():
    ORP = pd.read_csv(f)
else:
    q = {"where": "1=1", "returnGeometry": "false", "f": "json"}
    orp = pd.DataFrame([x["attributes"] for x in requests.get(
        f"{ARCGIS}/14/query", params={**q, "outFields": "nazev,okres"}, timeout=300
    ).json()["features"]])
    okr = pd.DataFrame([x["attributes"] for x in requests.get(
        f"{ARCGIS}/15/query", params={**q, "outFields": "kod,nutslau"}, timeout=300
    ).json()["features"]])
    ORP = (orp.merge(okr, left_on="okres", right_on="kod")
              .assign(lau=lambda t: t.nutslau.str[:6])
              .rename(columns={"nazev": "orp"})[["orp", "lau"]])
    ORP.to_csv(f, index=False)
ORP["kraj"] = ORP.lau.str[:5]

COV_45 = ["45-49", "50-54", "55-59", "60-64", "65-69", "70-74", "75-79", "80+"]
cov = pd.read_csv(F_COVID)
cov = cov[(cov.pohlavi == "Z") & cov.vekova_skupina.isin(COV_45)
          & (cov.orp_bydliste_kod > 0)                     # 0 = nezařazení (vč. Prahy)
          & (cov.orp_bydliste != "cizinci")].copy()        # bez bydliště v ČR
# kód ORP v sadě MZ začíná dvojčíslím kraje (2001 = Benešov, CZ020); názvy ORP
# nejsou celostátně jedinečné, proto párujeme přes název + kraj
cov["kraj"] = "CZ0" + cov.orp_bydliste_kod.astype(int).astype(str).str[:2]
cov = cov.merge(ORP, left_on=["orp_bydliste", "kraj"], right_on=["orp", "kraj"], how="left")
chybi = cov[cov.lau.isna()].orp_bydliste.unique()
assert not len(chybi), f"ORP bez okresu: {chybi}"

davky = cov.pivot_table(index="lau", columns="poradi_davky", values="pocet_davek",
                        aggfunc="sum")
zeny21 = D[(D.rok == 2021) & (D.band == TOTAL)].set_index("lau").zeny
OCK["covid_1_zeny45"] = 100 * davky[1] / zeny21
OCK["covid_3_zeny45"] = 100 * davky[3] / zeny21

print(f"{cov.orp_bydliste.nunique()} ORP → {cov.lau.nunique()} okresů")
OCK.assign(okres=lambda t: t.index.map(OKRES)).describe().round(1)

205 ORP → 76 okresů


,chripka65_pred,chripka65_po,chripka65_zmena,chripka_pred,chripka_po,chripka_zmena,covid_1_zeny45,covid_3_zeny45
count,77.0,77.0,77.0,77.0,77.0,77.0,76.0,76.0
mean,20.8,24.1,3.3,4.9,6.6,1.7,82.8,64.1
std,3.0,3.0,1.5,0.8,0.9,0.5,3.5,4.1
min,12.9,17.9,0.3,3.0,4.9,0.8,74.5,52.7
25%,18.9,22.5,2.3,4.3,6.0,1.4,80.9,61.7
50%,20.6,24.1,3.4,4.8,6.4,1.7,82.8,63.9
75%,22.1,25.3,4.1,5.4,7.1,1.9,85.7,67.4
max,31.1,34.5,7.0,7.0,9.3,2.8,89.2,71.5


In [40]:
POPIS_OCK = {
    "chripka65_pred":  ("chřipka 65+, před covidem", "%"),
    "chripka65_po":    ("chřipka 65+, po covidu", "%"),
    "chripka65_zmena": ("chřipka 65+, změna po − před", "p. b."),
    "chripka_pred":    ("chřipka všechny věky, před covidem", "%"),
    "chripka_po":      ("chřipka všechny věky, po covidu", "%"),
    "chripka_zmena":   ("chřipka všechny věky, změna", "p. b."),
    "covid_1_zeny45":  ("covid, 1. dávka, ženy 45+", "%"),
    "covid_3_zeny45":  ("covid, 3. dávka, ženy 45+", "%"),
}
OCKV = list(POPIS_OCK)
XO = X.merge(OCK.rename_axis("lau").reset_index(), on="lau")

rows = []
for c in OCKV:
    g = XO.dropna(subset=[c])
    rm, pm = stats.pearsonr(g[c], g.mamo_2y)
    rp, pp = stats.pearsonr(g[c], g.prev)
    rw, pw, _ = wcorr(g[c], g.mamo_2y, g.zeny)
    rows.append({"ukazatel": POPIS_OCK[c][0], "kod": c, "n": len(g),
                 "r_mamograf": rm, "p_mamograf": pm,
                 "r_mamograf_vazene": rw, "p_mamograf_vazene": pw,
                 "r_prevence": rp, "p_prevence": pp})
KORO = pd.DataFrame(rows)
for s_ in ("mamograf", "mamograf_vazene", "prevence"):
    KORO[f"q_{s_}"] = bh(KORO[f"p_{s_}"])
KORO.to_csv(OUT / "korelace_ockovani.csv", index=False)

# jak spolu souvisí očkování samo: drží okresy pořadí před a po covidu?
g = XO.dropna(subset=["chripka65_pred", "chripka65_po", "covid_3_zeny45"])
print("vztahy mezi očkováními (Pearson r):")
for a, b in [("chripka65_pred", "chripka65_po"), ("chripka65_pred", "covid_3_zeny45"),
             ("chripka65_po", "covid_3_zeny45"), ("chripka65_zmena", "covid_3_zeny45")]:
    print(f"  {POPIS_OCK[a][0]:<32} × {POPIS_OCK[b][0]:<30} r = {stats.pearsonr(g[a], g[b])[0]:+.2f}")
print()
KORO[["ukazatel", "n", "r_mamograf", "p_mamograf", "q_mamograf",
      "r_mamograf_vazene", "q_mamograf_vazene", "r_prevence", "q_prevence"]].round(3)

vztahy mezi očkováními (Pearson r):
  chřipka 65+, před covidem        × chřipka 65+, po covidu         r = +0.89
  chřipka 65+, před covidem        × covid, 3. dávka, ženy 45+      r = +0.18
  chřipka 65+, po covidu           × covid, 3. dávka, ženy 45+      r = +0.47
  chřipka 65+, změna po − před     × covid, 3. dávka, ženy 45+      r = +0.61



,ukazatel,n,r_mamograf,p_mamograf,q_mamograf,r_mamograf_vazene,q_mamograf_vazene,r_prevence,q_prevence
0,"chřipka 65+, před covidem",77,0.115,0.317,0.443,0.134,0.567,0.354,0.004
1,"chřipka 65+, po covidu",77,0.111,0.336,0.443,-0.038,0.823,0.389,0.002
2,"chřipka 65+, změna po − před",77,-0.004,0.970,0.970,-0.283,0.400,0.085,0.526
3,"chřipka všechny věky, před covidem",77,0.116,0.314,0.443,0.215,0.400,0.308,0.013
4,"chřipka všechny věky, po covidu",77,0.155,0.179,0.443,0.079,0.731,0.400,0.002
5,"chřipka všechny věky, změna",77,0.100,0.388,0.443,-0.177,0.467,0.244,0.052
6,"covid, 1. dávka, ženy 45+",76,0.197,0.088,0.443,0.182,0.400,-0.102,0.508
7,"covid, 3. dávka, ženy 45+",76,0.184,0.112,0.443,0.165,0.400,-0.033,0.779


In [41]:
ock = go.Figure()
k_ = KORO.iloc[::-1]                          # první ukazatel nahoře
for col, barva, jmeno in [("r_mamograf", S1, "mamografický screening"),
                          ("r_prevence", S2, "preventivní prohlídky")]:
    ock.add_trace(go.Bar(
        y=k_.ukazatel, x=k_[col], orientation="h", name=jmeno,
        marker=dict(color=barva, line=dict(color=SURFACE, width=2)),
        customdata=np.c_[k_[col.replace("r_", "p_")], k_[col.replace("r_", "q_")], k_.n],
        hovertemplate=("<b>%{y}</b><br>r = %{x:.3f}<br>p = %{customdata[0]:.3f}"
                       "<br>q (BH) = %{customdata[1]:.3f}<br>n = %{customdata[2]}"
                       "<extra></extra>")))
nq = int((KORO.q_mamograf < 0.05).sum())
ock.update_layout(**layout(
    "Očkování a pokrytí screeningem",
    f"Pearsonovo r · pokrytí průměrované za 2020–2024 · 77 okresů (covid 76, bez Prahy) · "
    f"po korekci BH je u mamografie průkazných {nq} z {len(KORO)} ukazatelů"))
ock.update_layout(height=560, margin=dict(l=250, r=40, t=100, b=90),
                  barmode="group", bargap=0.24, bargroupgap=0.12,
                  xaxis=dict(title="Pearsonovo r", range=[-0.6, 0.6],
                             gridcolor=GRID, zeroline=True, zerolinecolor=AXIS,
                             zerolinewidth=1, tickfont=dict(color=MUTED)),
                  yaxis=dict(tickfont=dict(size=11.5, color=INK2), showgrid=False),
                  legend=dict(orientation="h", y=-0.10, yanchor="top", x=0))
ock.write_html(OUT / "ockovani_korelace.html", include_plotlyjs="cdn")
ock

In [42]:
osc = go.Figure()
buttons = []
for i, c in enumerate(OCKV):
    g = XO.dropna(subset=[c])
    r, pv = stats.pearsonr(g[c], g.mamo_2y)
    k = np.polyfit(g[c], g.mamo_2y, 1)
    xs = np.linspace(g[c].min(), g[c].max(), 2)
    for má, barva, jmeno in [(True, S1, "má vlastní pracoviště"),
                             (False, S2, "bez vlastního pracoviště")]:
        gg = g[g.vlastni_pracoviste == má]
        osc.add_trace(go.Scatter(
            x=gg[c], y=gg.mamo_2y, mode="markers", name=jmeno, visible=(i == 0),
            legendgroup=jmeno, showlegend=(i == 0),
            marker=dict(size=9, color=barva, line=dict(color=SURFACE, width=2), opacity=0.9),
            customdata=np.c_[gg.okres, gg.kraj, gg.prev],
            hovertemplate=("<b>%{customdata[0]}</b> · %{customdata[1]}<br>"
                           "očkování: %{x:.1f}<br>mamograf: %{y:.1f} %<br>"
                           "prevence: %{customdata[2]:.1f} %<extra></extra>")))
    osc.add_trace(go.Scatter(x=xs, y=np.polyval(k, xs), mode="lines", visible=(i == 0),
                             name="lineární proložení", legendgroup="fit",
                             showlegend=(i == 0), line=dict(color=MUTED, width=2),
                             hoverinfo="skip"))
    buttons.append(dict(label=POPIS_OCK[c][0], method="update", args=[
        {"visible": [j // 3 == i for j in range(3 * len(OCKV))]},
        {"title.text": (f"<b>{POPIS_OCK[c][0]} vs. mamografický screening</b>"
                        f'<br><span style="font-size:12px;color:{INK2}">'
                        f"Pearson r = {r:.2f} (p = {pv:.3f}) · {len(g)} okresů · "
                        f"pokrytí 2020–2024</span>"),
         "xaxis.title.text": f"{POPIS_OCK[c][0]} [{POPIS_OCK[c][1]}]"}]))

c0 = OCKV[0]
g0 = XO.dropna(subset=[c0])
r0, p0 = stats.pearsonr(g0[c0], g0.mamo_2y)
osc.update_layout(**layout(f"{POPIS_OCK[c0][0]} vs. mamografický screening",
                           f"Pearson r = {r0:.2f} (p = {p0:.3f}) · {len(g0)} okresů · "
                           f"pokrytí 2020–2024"))
osc.update_layout(
    height=580, margin=dict(l=60, r=30, t=100, b=130),
    xaxis_title=f"{POPIS_OCK[c0][0]} [{POPIS_OCK[c0][1]}]",
    yaxis_title="mamografický screening [% za 2 roky]",
    legend=dict(orientation="h", y=-0.20, yanchor="top", x=0),
    updatemenus=[dict(type="dropdown", x=1.0, xanchor="right", y=1.16, yanchor="top",
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12), showactive=True, buttons=buttons)])
osc.write_html(OUT / "ockovani_scatter.html", include_plotlyjs="cdn")
osc

In [43]:
omap = XO.set_index("lau").reindex(LAUS)

def ock_cdata(c):
    return np.c_[omap.okres, omap.kraj, [cz(v) for v in omap[c]],
                 [cz(v) for v in omap.mamo_2y], [cz(v) for v in omap.prev]]

def ock_htmpl(c):
    jm, jed = POPIS_OCK[c]
    return (f"<b>%{{customdata[0]}}</b> · %{{customdata[1]}}<br>"
            f"<span style='color:{MUTED}'>{jm}</span><br><br>"
            f"Očkování: <b>%{{customdata[2]}} {jed}</b><br><br>"
            "Mamograf (2 roky): %{customdata[3]} %<br>"
            "Preventivní prohlídka: %{customdata[4]} %<extra></extra>")

def ock_skala(c):
    jm, jed = POPIS_OCK[c]
    return [f"{jm}<br>[{jed}]"], [f" {jed}" if jed != "%" else " %"]

c0 = OCKV[0]
omapa = go.Figure()
# šedý podklad: okresy bez hodnoty (Praha u covidu) jinak zmizí z mapy
omapa.add_trace(go.Choropleth(
    geojson=GEO, locations=LAUS, z=np.zeros(len(LAUS)), showscale=False,
    colorscale=[[0, GRID], [1, GRID]], marker_line_color=SURFACE, marker_line_width=0.8,
    hovertemplate="<b>Praha</b><br>bez dat: bydliště v Praze je ve covidové sadě "
                  "„nezařazeno“<extra></extra>", showlegend=False))
omapa.add_trace(go.Choropleth(
    geojson=GEO, locations=LAUS, z=omap[c0],
    customdata=ock_cdata(c0), hovertemplate=ock_htmpl(c0),
    colorscale=BLUES, marker_line_color=SURFACE, marker_line_width=0.8,
    zmin=float(np.floor(omap[c0].min())), zmax=float(np.ceil(omap[c0].max())),
    colorbar=skala(f"{POPIS_OCK[c0][0]}<br>[{POPIS_OCK[c0][1]}]"), showlegend=False))
omapa.add_trace(pracoviste())

omapa.update_layout(**layout("Očkování proti chřipce a covidu podle okresů",
                             "ÚZIS NR-28-02 a MZ ČR · rozbalovací seznam mění ukazatel · "
                             "škála se přepočítává pro každý ukazatel"))
mapa_geo(omapa)
omapa.update_layout(
    height=600, margin=dict(l=10, r=10, t=100, b=20),
    showlegend=True, legend=LEGENDA_MAPA,
    updatemenus=[dict(type="dropdown", x=1.0, xanchor="right", y=1.13, yanchor="top",
                      bgcolor=SURFACE, bordercolor=AXIS, borderwidth=1,
                      font=dict(size=12), showactive=True,
                      buttons=[dict(label=POPIS_OCK[c][0], method="restyle", args=[{
                          "z": [omap[c]], "customdata": [ock_cdata(c)],
                          "hovertemplate": [ock_htmpl(c)],
                          "zmin": [float(np.floor(omap[c].min()))],
                          "zmax": [float(np.ceil(omap[c].max()))],
                          "colorbar.title.text": ock_skala(c)[0],
                          "colorbar.ticksuffix": ock_skala(c)[1]},
                          [1]])                  # jen choropleta s daty
                               for c in OCKV])])
omapa.write_html(OUT / "mapa_ockovani.html", include_plotlyjs="cdn")
omapa

**Jak to číst.**

* **Očkování mamografické pokrytí nevysvětluje.** U všech osmi ukazatelů je
  korelace se screeningem slabá (r mezi 0 a 0,2) a po korekci BH neprůkazná,
  nevážená i vážená počtem žen. Nejblíž má covid (1. dávka, r ≈ 0,20; p ≈ 0,09),
  ani to ale korekci nepřežije.
* **S preventivními prohlídkami chřipka souvisí.** Okresy s vyšší proočkovaností
  proti chřipce mají i vyšší účast na prohlídkách u praktika (r ≈ 0,3–0,4,
  q < 0,02), a to před covidem i po něm. Dává to smysl: na chřipku očkuje hlavně
  praktický lékař, takže oba ukazatele měří, jak aktivní jsou praktici v okrese.
  Covid s prevencí nesouvisí (r ≈ 0), protože se očkovalo hlavně v očkovacích
  centrech, mimo praktiky.
* **Covid okresy u chřipky skoro nepřeskládal.** Pořadí okresů v proočkovanosti
  65+ před a po covidu drží (r = 0,89). Kde se lidé víc očkovali proti covidu
  (3. dávka), tam ale chřipka po covidu rostla rychleji (r = 0,61). Před covidem
  přitom vztah mezi „chřipkovými“ a „covidovými“ okresy skoro nebyl (r = 0,18).
* Mamografický screening tedy stojí stranou od obou typů očkování i od prohlídek
  u praktika. Zve na něj jiný kanál (gynekolog, zvací dopisy pojišťoven), takže
  na aktivitě praktiků nezávisí. Kap. 8 to potvrzuje: pokrytí jde ruku v ruce
  s preventivními prohlídkami u gynekologa (r = 0,46).

## 10 · Korelační matice všech proměnných

Všechny proměnné z notebooku v jedné matici: obě metriky pokrytí, socioekonomické
ukazatele z kap. 8 a očkování z kap. 9. Hodnota v buňce je Pearsonovo *r* mezi
okresy (77 okresů, u covidu 76 bez Prahy). Modrá znamená kladný vztah, červená
záporný, šedá žádný. Tenké čáry oddělují tematické skupiny. V hoveru je *r*, *p*
a počet okresů. Při 1 431 dvojicích je *p* < 0,05 čistě náhodou zhruba u 72 z nich,
takže jednotlivé „průkazné“ buňky berte jako tipy, ne jako závěry.

In [44]:
SKUPINY = [
    ("pokrytí",           ["mamo_2y", "prev"]),
    ("vzdělání a práce",  ["vs_zeny_pct", "zakl_vzd_zeny_pct", "nezam_zeny_pct",
                           "mimo_pracovni_silu_zeny_pct"]),
    ("sociální situace",  ["davky_ssp_Kc_obyv", "prisp_bydleni_Kc_obyv",
                           "invalid_duchod_zeny_pct", "mimo_byty_pct", "cizinky_pct"]),
    ("bydlení a hustota", ["cena_byt_Kc_m2", "cena_dum_Kc_m2", "hustota_obyv_km2"]),
    ("demografie",        ["prumerny_vek_zeny", "podil_65plus_zeny", "vdovy_rozvedene_pct",
                           "migrace_na_1000",
                           "umrti_novotvary_zeny_pct"]),
    ("velikost obcí",     [f"obce_{i}_pct" for i in range(5)]),
    ("dostupnost a péče", ["ma_mamocentrum", "vzdalenost_km", "dojizdka_mamo_pct",
                           "gyn_prevence_pct", "vykony_na_obyv"]),
    ("prs a screeningy",  ["diag_prs_na100", "nezhoubne_prs_na1000", "rakovina_prs_na1000",
                           "cytologie_pct", "toks_pct"]),
    ("nemocnost",         ["diabetes_pct", "hypertenze_pct", "chopn_pct", "deprese_pct",
                           "obezita_pct"]),
    ("volby 2025",        [c for c in POPIS if c.startswith("volby_")]),
    ("očkování",          OCKV),
]
JMENO = {**{c: v[0] for c, v in POPIS.items()}, **{c: v[0] for c, v in POPIS_OCK.items()},
         "mamo_2y": "POKRYTÍ: mamografický screening", "prev": "POKRYTÍ: preventivní prohlídky"}
VSE = [c for _, cs in SKUPINY for c in cs if c in XO.columns]
nepouzite = set(KOVARIATY + OCKV) - set(VSE)
assert not nepouzite, f"proměnné mimo skupiny: {nepouzite}"

R = XO[VSE].corr()                                   # párově, NaN se vynechávají
n_ = len(VSE)
P = np.full((n_, n_), np.nan); N = np.zeros((n_, n_), int)
for a in range(n_):
    for b in range(a + 1, n_):
        g = XO[[VSE[a], VSE[b]]].dropna()
        P[a, b] = P[b, a] = stats.pearsonr(g.iloc[:, 0], g.iloc[:, 1])[1]
        N[a, b] = N[b, a] = len(g)
R.rename(index=JMENO, columns=JMENO).round(3).to_csv(OUT / "korelacni_matice.csv")

jm = [JMENO[c] for c in VSE]
Z = R.values.copy(); np.fill_diagonal(Z, np.nan)    # diagonála (r = 1) jen ruší
hover = [[(f"<b>{jm[a]}</b><br><b>{jm[b]}</b><br><br>r = {cz(Z[a, b], 2)}"
           f"<br>p = {cz(P[a, b], 3)}<br>okresů: {N[a, b]}") if a != b else jm[a]
          for b in range(n_)] for a in range(n_)]

mat = go.Figure(go.Heatmap(
    z=Z, x=jm, y=jm, text=hover, hovertemplate="%{text}<extra></extra>",
    colorscale=DIV, zmin=-1, zmax=1, xgap=1, ygap=1,
    colorbar=dict(title=dict(text="Pearsonovo r", side="top",
                             font=dict(size=11, color=INK2)),
                  thickness=12, len=0.5, outlinewidth=0, tickvals=[-1, -0.5, 0, 0.5, 1],
                  ticktext=["−1", "−0,5", "0", "0,5", "1"],
                  tickfont=dict(size=11, color=MUTED))))

# hranice tematických skupin
hr, i0 = [], 0
for _, cs in SKUPINY:
    i0 += len([c for c in cs if c in VSE])
    hr.append(i0 - 0.5)
for h in hr[:-1]:
    for kw in (dict(x0=h, x1=h, y0=-0.5, y1=n_ - 0.5), dict(y0=h, y1=h, x0=-0.5, x1=n_ - 0.5)):
        mat.add_shape(type="line", line=dict(color=INK2, width=1.2), **kw)

mat.update_layout(**layout("Korelační matice všech proměnných",
                           f"Pearsonovo r · {n_} proměnných · 77 okresů (covid 76) · "
                           "pokrytí průměrované za 2020–2024"))
mat.update_layout(
    height=1250, width=1250, margin=dict(l=280, r=40, t=90, b=280),
    plot_bgcolor=SURFACE,
    xaxis=dict(tickangle=-60, tickfont=dict(size=10.5, color=INK2), showgrid=False,
               ticks="", linecolor=SURFACE, constrain="domain"),
    yaxis=dict(autorange="reversed", tickfont=dict(size=10.5, color=INK2),
               showgrid=False, ticks="", linecolor=SURFACE,
               scaleanchor="x", constrain="domain"))
mat.write_html(OUT / "korelacni_matice.html", include_plotlyjs="cdn")
mat

In [45]:
# nejsilnější vztahy v matici (bez dvojic uvnitř téže skupiny „velikost obcí“ a voleb,
# které spolu souvisejí z definice)
skup = {c: s for s, cs in SKUPINY for c in cs}
par = [(VSE[a], VSE[b], R.values[a, b], P[a, b], N[a, b])
       for a in range(n_) for b in range(a + 1, n_)]
PARY = pd.DataFrame(par, columns=["a", "b", "r", "p", "n"])
PARY["q"] = bh(PARY.p)
PARY["stejna_skupina"] = PARY.a.map(skup) == PARY.b.map(skup)
for c in ("a", "b"):
    PARY[c] = PARY[c].map(JMENO)
print(f"{len(PARY)} dvojic, po korekci BH průkazných {int((PARY.q < 0.05).sum())}")
# q z 1 431 dvojic je mírnější než v kap. 8.2 (mnoho skutečných vztahů mezi kovariátami
# „rozředí“ korekci), pro vztahy s pokrytím proto platí q z kap. 8.2 a 9
print("\nVztahy s pokrytím mamografií, seřazeno podle |r|:")
print(PARY[PARY.a.str.contains("mamografický screening") & ~PARY.stejna_skupina]
      .reindex(columns=["b", "r", "p", "n"]).sort_values("r", key=abs, ascending=False)
      .head(10).round(3).to_string(index=False))
print("\nNejsilnější vztahy napříč skupinami:")
PARY[~PARY.stejna_skupina].sort_values("r", key=abs, ascending=False).head(15).round(3)

1431 dvojic, po korekci BH průkazných 466

Vztahy s pokrytím mamografií, seřazeno podle |r|:
                                         b      r     p  n
preventivní gynekologická prohlídka za rok  0.463 0.000 77
           test na okultní krvácení za rok  0.404 0.000 77
          cytologie děložního čípku za rok  0.374 0.001 77
                      léčená rakovina prsu  0.297 0.009 77
   mamografie mimo okres bydliště (měřeno) -0.295 0.009 77
                           volby 2025: SPD -0.288 0.011 77
                  hypertenze (dolní odhad)  0.254 0.026 77
                   ženy s cizím občanstvím -0.230 0.045 77
          okres má mamografické pracoviště  0.200 0.081 77
                 covid, 1. dávka, ženy 45+  0.197 0.088 76

Nejsilnější vztahy napříč skupinami:


,a,b,r,p,n,q,stejna_skupina
599,kupní cena domů,volby 2025: Piráti,0.885,0.0,77,0.0,False
144,"vysokoškolačky, ženy 15+",volby 2025: Piráti,0.877,0.0,77,0.0,False
114,"vysokoškolačky, ženy 15+",kupní cena domů,0.867,0.0,77,0.0,False
558,kupní cena bytů,volby 2025: Piráti,0.867,0.0,77,0.0,False
113,"vysokoškolačky, ženy 15+",kupní cena bytů,0.856,0.0,77,0.0,False
191,"jen základní vzdělání, ženy 15+",volby 2025: ANO,0.843,0.0,77,0.0,False
259,ženy mimo pracovní sílu,ženy s cizím občanstvím,-0.819,0.0,77,0.0,False
192,"jen základní vzdělání, ženy 15+",volby 2025: SPOLU,-0.806,0.0,77,0.0,False
142,"vysokoškolačky, ženy 15+",volby 2025: SPOLU,0.803,0.0,77,0.0,False
261,ženy mimo pracovní sílu,kupní cena domů,-0.795,0.0,77,0.0,False


## 11 · Co z toho plyne

*(hodnoty se dopočítají při spuštění — text níže popisuje, co v datech vyšlo)*

In [46]:
g = d[d.band == TOTAL]
nej, nejh = g.nlargest(3, "mamo_2y"), g.nsmallest(3, "mamo_2y")
print(f"""
POKRYTÍ MAMOGRAFIÍ (ženy 45+, 2 roky, {ROK})
  ČR celkem            {100*(D[(D.rok==ROK)&(D.band==TOTAL)].pocet_vysetreni.sum()
                             + D[(D.rok==ROK)&(D.band==TOTAL)].mamo_predchozi.sum())
                            / D[(D.rok==ROK)&(D.band==TOTAL)].zeny.sum():.1f} %
  nejvyšší             {', '.join(f'{r.okres} {r.mamo_2y:.1f} %' for r in nej.itertuples())}
  nejnižší             {', '.join(f'{r.okres} {r.mamo_2y:.1f} %' for r in nejh.itertuples())}
  rozpětí okresů       {g.mamo_2y.min():.1f} – {g.mamo_2y.max():.1f} % ({g.mamo_2y.max()/g.mamo_2y.min():.1f}×)

VĚKOVÝ PROFIL (pokrytí mamografií za 2 roky)
""".rstrip())
prof = (D[D.rok == ROK].groupby("band", observed=True)
          .apply(lambda x: pd.Series({
              "mamograf 2 roky %": 100*(x.pocet_vysetreni.sum()+x.mamo_predchozi.sum())/x.zeny.sum(),
              "prevence %": 100*x.pocet_vysetrenych.sum()/x.populace.sum()}),
                 include_groups=False).round(1))
print(prof.to_string())
print(f"""
KORELACE PREVENCE × MAMOGRAF
  45+ celkem           r = {KOR.loc[0, 'Pearson r']:.2f} (p = {KOR.loc[0, 'p']:.2f})
  rozpětí po pásmech   r = {KOR['Pearson r'].min():.2f} – {KOR['Pearson r'].max():.2f}
  → okres, kde ženy chodí na prevenci, není okresem, kde chodí na mamograf

DOSTUPNOST
  okresů bez pracoviště {int((~NEJ.vlastni_pracoviste).sum())} ze 77
  vzdálenost × pokrytí  r = {stats.pearsonr(g.nej_km, g.mamo_2y)[0]:.2f} \
(p = {stats.pearsonr(g.nej_km, g.mamo_2y)[1]:.2f})
  → geografická dostupnost není hlavní brzda

OČKOVÁNÍ × MAMOGRAF (pokrytí 2020–2024)
  chřipka 65+ před/po   r = {KORO.set_index('kod').r_mamograf['chripka65_pred']:.2f} / \
{KORO.set_index('kod').r_mamograf['chripka65_po']:.2f}
  covid 1. / 3. dávka   r = {KORO.set_index('kod').r_mamograf['covid_1_zeny45']:.2f} / \
{KORO.set_index('kod').r_mamograf['covid_3_zeny45']:.2f}
  průkazných po BH      {int((KORO.q_mamograf < 0.05).sum())} z {len(KORO)}
  → chřipka jde s prevencí u praktika, ne se screeningem
""")


POKRYTÍ MAMOGRAFIÍ (ženy 45+, 2 roky, 2024)
  ČR celkem            55.4 %
  nejvyšší             Třebíč 67.0 %, Kroměříž 66.2 %, Olomouc 64.9 %
  nejnižší             Jeseník 39.8 %, Cheb 41.8 %, Semily 46.9 %
  rozpětí okresů       39.8 – 67.0 % (1.7×)

VĚKOVÝ PROFIL (pokrytí mamografií za 2 roky)
            mamograf 2 roky %  prevence %
band                                     
45+ celkem               55.4        59.9
45–49                    61.1        57.6
50–54                    61.7        60.6
55–59                    60.7        60.5
60–64                    61.9        60.4
65–69                    62.8        64.2
70–74                    59.3        63.6
75–79                    49.3        60.5
80–84                    31.2        55.5
85+                      10.1        49.3

KORELACE PREVENCE × MAMOGRAF
  45+ celkem           r = 0.12 (p = 0.30)
  rozpětí po pásmech   r = 0.07 – 0.22
  → okres, kde ženy chodí na prevenci, není okresem, kde chodí na mamograf

DOSTUPN

## 12 · Metodické poznámky a omezení

1. **Dojížďka v hoveru map je model, v kap. 8 měření.** Podíly v hoveru pocházejí
   z gravitačního modelu nad seznamem pracovišť (kap. 5). Skutečné toky
   *okres bydliště → okres zařízení* přinesla až sada NR-04-86 (kap. 8.0).
   S modelem souhlasí dobře (r = 0,77 v podílu mamografií mimo vlastní okres),
   do korelací a modelů jde měřená hodnota. NR-04-86 ale nemá pohlaví ani věk, takže
   ukazatele z ní platí pro všechny pacientky, ne jen pro ženy 45+, a kódy výkonů
   (89223, 63050) jsme určili podle diagnóz a objemů, ne z číselníku.

2. **Dva různé geografické klíče.** PPS-01-02 (mamografie) je členěná podle
   **bydliště** pojištěnky, PPS-08-04 (prevence) podle **okresu pracoviště praktického
   lékaře**. Pro mamografii proto používáme jako jmenovatel rezidentky (ČSÚ), pro
   prevenci kapitační populaci — každá metrika je tak vnitřně konzistentní, ale
   vzájemná korelace srovnává dvě ne zcela totožné populace. Sloupec
   `kapitace_index` ukazuje, kde je rozdíl největší; omezení na okresy s indexem
   0,9–1,1 korelaci mírně posiluje, ale nemění závěr.

3. **Dvouleté okno může přestřelit.** Žena vyšetřená dva roky po sobě se do
   dvouletého součtu započítá dvakrát. Pokrytí spočtené z unikátních pojištěnek
   (jak ho publikuje ÚZIS) bývá o několik procentních bodů nižší.

4. **Screening má cílovou skupinu 45+ bez horní hranice**, ale u nejstarších pásem
   klesá indikace k vyšetření; nízké hodnoty u 80–84 a 85+ nejsou samy o sobě
   selhání programu.

5. **Dodaný ČSÚ soubor** (třetí CSV) je jen za ČR a kraje, k 31. 12. 2025, bez
   rozpadu na pohlaví. V notebooku slouží jako kontrolní součet; okresní jmenovatel
   se stahuje z téže sady `OBY02D` přes API (střední stav k 1. 7., ženy).

6. **Barevná škála hlavní mapy se mění s věkovým pásmem.** Rozsah je vždy v popisku
   škály; mezi pásmy proto hodnoty neporovnávejte podle odstínu, ale podle čísla
   v hoveru nebo v tabulce. Mapa vývoje v čase má škálu pevnou.

7. **Zdroje a licence.** ÚZIS ČR — otevřená data Programu prevence a screeningu;
   ČSÚ — DataStat, sada `OBY02D`; ČÚZK — RÚIAN (hranice okresů);
   Národní screeningové centrum — mamo.cz (seznam pracovišť).
   Data stažená z API jsou uložená v `data/`, výstupy v `outputs/`.